In [ ]:
# Testování dotazů do KN podle [katastrální území] [parc.č.]
#/////////////////////////////////////////////////////////////////////////////////////////
#/////////////////////////////////////////////////////////////////////////////////////////

import requests
from lxml import etree
from pyproj import Transformer
import pandas as pd
import os

# ==============================================================================
# 1. Funkce pro získání kódu katastrálního území (UPPER_ZONING_ID) podle názvu
# ==============================================================================
def get_zoning_code(zoning_name):
    """
    Na základě názvu katastrálního území získá identifikační kód (UPPER_ZONING_ID)
    pomocí uloženého dotazu GetZoningByName.
    """
    base_url = "https://services.cuzk.cz/wfs/inspire-CP-wfs.asp?"
    params = {
        "service": "WFS",
        "version": "2.0.0",
        "request": "GetFeature",
        "storedQuery_id": "GetZoningByName",
        "ZONING_NAME": zoning_name
    }
    print(f"\nDotazuji katastrální území (GetZoningByName) pro: {zoning_name}")
    response = requests.get(base_url, params=params)
    print("HTTP status kód (GetZoningByName):", response.status_code)
    
    # Uložení odpovědi pro případnou analýzu
    filename = "zoning_response.xml"
    with open(filename, "wb") as f:
        f.write(response.content)
    print(f"XML odpověď (GetZoningByName) byla uložena do souboru: {os.path.abspath(filename)}")
    
    try: 
        tree = etree.fromstring(response.content)
    except Exception as e:
        raise Exception(f"Chyba při parsování XML odpovědi (GetZoningByName): {e}")
    
    ns = {
        "CP": "http://inspire.ec.europa.eu/schemas/cp/4.0",
        "base": "http://inspire.ec.europa.eu/schemas/base/3.3",
        "wfs": "http://www.opengis.net/wfs/2.0"
    }
    # Vyhledání identifikátoru katastrálního území v elementu CP:CadastralZoning/CP:inspireId/base:Identifier/base:localId
    zoning_id_elem = tree.find(".//CP:CadastralZoning/CP:inspireId/base:Identifier/base:localId", namespaces=ns)
    if zoning_id_elem is not None and zoning_id_elem.text:
        zoning_id_full = zoning_id_elem.text.strip()
        print("Nalezený identifikátor (full):", zoning_id_full)
        zoning_id = zoning_id_full[3:] if zoning_id_full.startswith("CZ.") else zoning_id_full
        print("Vyhodnocený kód katastrálního území (UPPER_ZONING_ID):", zoning_id)
        return zoning_id
    else:
        print("Nebyl nalezen identifikátor katastrálního území v odpovědi.")
        return None

# ==============================================================================
# 2. Funkce pro získání dat o parcele a vytvoření DataFrame
# ==============================================================================
def get_parcel_data(zoning_name, parcel_number):
    """
    Na základě názvu katastrálního území a parcelního čísla získá podrobné informace o parcele.
    Nejprve získá kód katastrálního území, poté zavolá storedQuery GetParcel.
    Z odpovědi extrahuje informace a uloží je do pandas DataFrame vhodného pro import do DB.
    """
    # Získání kódu katastrálního území
    upper_zoning_id = get_zoning_code(zoning_name)
    if not upper_zoning_id:
        raise Exception("Nepodařilo se získat kód katastrálního území.")
    
    base_url = "https://services.cuzk.cz/wfs/inspire-CP-wfs.asp?"
    params = {
        "service": "WFS",
        "version": "2.0.0",
        "request": "GetFeature",
        "storedQuery_id": "GetParcel",
        "UPPER_ZONING_ID": upper_zoning_id,
        "TEXT": parcel_number
    }
    
    print("\nSestavuji dotaz pomocí storedQuery 'GetParcel'...")
    print("Základní URL:", base_url)
    print("Parametry:")
    for k, v in params.items():
        print(f"  {k}: {v}")
    
    response = requests.get(base_url, params=params)
    print("\nHTTP status kód odpovědi (GetParcel):", response.status_code)
    
    filename = "parcel_response.xml"
    with open(filename, "wb") as f:
        f.write(response.content)
    print(f"XML odpověď (GetParcel) byla uložena do souboru: {os.path.abspath(filename)}")
    
    try:
        tree = etree.fromstring(response.content)
    except Exception as e:
        raise Exception(f"Chyba při parsování XML odpovědi (GetParcel): {e}")
    
    fc = tree.xpath("/wfs:FeatureCollection", namespaces={"wfs": "http://www.opengis.net/wfs/2.0"})
    if fc:
        fc_elem = fc[0]
        num_matched = fc_elem.get("numberMatched", "není uvedeno")
        num_returned = fc_elem.get("numberReturned", "není uvedeno")
        print("\nFeatureCollection:")
        print("  numberMatched =", num_matched)
        print("  numberReturned =", num_returned)
    else:
        print("Element FeatureCollection nebyl nalezen.")
    
    # Rozšířený slovník jmenných prostorů – zahrnujeme i "base"
    ns = {
        "wfs": "http://www.opengis.net/wfs/2.0",
        "gml": "http://www.opengis.net/gml/3.2",
        "CP": "http://inspire.ec.europa.eu/schemas/cp/4.0",
        "base": "http://inspire.ec.europa.eu/schemas/base/3.3"
    }
    
    members = tree.xpath("//wfs:member", namespaces=ns)
    print(f"\nNalezeno {len(members)} feature (member).")
    
    records = []
    
    for mem in members:
        parcel_elem = mem.find(".//CP:CadastralParcel", namespaces=ns)
        if parcel_elem is None:
            continue
        
        # gml:id z atributu CP:CadastralParcel
        gml_id = parcel_elem.get("{http://www.opengis.net/gml/3.2}id")
        
        # cp:areaValue
        area_elem = parcel_elem.find("CP:areaValue", namespaces=ns)
        try:
            area_val = float(area_elem.text.strip()) if area_elem is not None and area_elem.text else None
        except ValueError:
            area_val = None
        
        # cp:beginLifespanVersion
        begin_elem = parcel_elem.find("CP:beginLifespanVersion", namespaces=ns)
        begin_val = begin_elem.text.strip() if begin_elem is not None and begin_elem.text else None
        
        # cp:endLifespanVersion
        end_elem = parcel_elem.find("CP:endLifespanVersion", namespaces=ns)
        end_val = end_elem.text.strip() if (end_elem is not None and end_elem.text) else None
        
        # cp:geometry – uložíme text z gml:posList uvnitř polygonu
        geom_elem = parcel_elem.find("CP:geometry/gml:Polygon/gml:exterior/gml:LinearRing/gml:posList", namespaces=ns)
        geometry_text = geom_elem.text.strip() if geom_elem is not None and geom_elem.text else None
        
        # cp:inspireId – získáme base:localId a base:namespace
        inspire_local = None
        inspire_namespace = None
        inspire_elem = parcel_elem.find("CP:inspireId/base:Identifier", namespaces=ns)
        if inspire_elem is not None:
            local_elem = inspire_elem.find("base:localId", namespaces=ns)
            ns_elem = inspire_elem.find("base:namespace", namespaces=ns)
            inspire_local = local_elem.text.strip() if local_elem is not None and local_elem.text else None
            inspire_namespace = ns_elem.text.strip() if ns_elem is not None and ns_elem.text else None
        
        # cp:label
        label_elem = parcel_elem.find("CP:label", namespaces=ns)
        label_val = label_elem.text.strip() if label_elem is not None and label_elem.text else None
        
        # cp:nationalCadastralReference
        ref_elem = parcel_elem.find("CP:nationalCadastralReference", namespaces=ns)
        ref_val = ref_elem.text.strip() if ref_elem is not None and ref_elem.text else None
        
        # cp:referencePoint – extrakce souřadnic z gml:Point/gml:pos
        ref_point_elem = parcel_elem.find("CP:referencePoint/gml:Point/gml:pos", namespaces=ns)
        if ref_point_elem is not None and ref_point_elem.text:
            coords = ref_point_elem.text.strip().split()
            if len(coords) >= 2:
                try:
                    x = float(coords[0])
                    y = float(coords[1])
                except ValueError:
                    x, y = None, None
            else:
                x, y = None, None
        else:
            x, y = None, None
        
        # cp:validFrom
        valid_from_elem = parcel_elem.find("CP:validFrom", namespaces=ns)
        valid_from_val = valid_from_elem.text.strip() if valid_from_elem is not None and valid_from_elem.text else None
        
        # cp:administrativeUnit – získáme hodnoty atributů xlink:href a xlink:title
        admin_elem = parcel_elem.find("CP:administrativeUnit", namespaces=ns)
        admin_href = admin_elem.get("{http://www.w3.org/1999/xlink}href") if admin_elem is not None else None
        admin_title = admin_elem.get("{http://www.w3.org/1999/xlink}title") if admin_elem is not None else None
        
        # cp:zoning – získáme hodnoty atributů xlink:href a xlink:title
        zoning_elem = parcel_elem.find("CP:zoning", namespaces=ns)
        zoning_href = zoning_elem.get("{http://www.w3.org/1999/xlink}href") if zoning_elem is not None else None
        zoning_title = zoning_elem.get("{http://www.w3.org/1999/xlink}title") if zoning_elem is not None else None
        
        # Transformace souřadnic z EPSG:5514 do EPSG:4326
        if x is not None and y is not None:
            transformer = Transformer.from_crs("EPSG:5514", "EPSG:4326", always_xy=True)
            lon, lat = transformer.transform(x, y)
        else:
            lon, lat = None, None
        
        record = {
            "kat_uzemi": zoning_name,
            "upper_zoning_id": upper_zoning_id,
            "parcel_number": parcel_number,
            "gml_id": gml_id,
            "areaValue_m2": area_val,
            "beginLifespanVersion": begin_val,
            "endLifespanVersion": end_val,
            "geometry": geometry_text,
            "inspire_localId": inspire_local,
            "inspire_namespace": inspire_namespace,
            "label": label_val,
            "nationalCadastralReference": ref_val,
            "refPoint_x": x,
            "refPoint_y": y,
            "refPoint_lon": lon,
            "refPoint_lat": lat,
            "validFrom": valid_from_val,
            "administrativeUnit_href": admin_href,
            "administrativeUnit_title": admin_title,
            "zoning_href": zoning_href,
            "zoning_title": zoning_title
        }
        records.append(record)
    
    if records:
        df = pd.DataFrame(records)
        print("\nDataFrame s informacemi o parcele:")
        print(df)
    else:
        print("Nebyly nalezeny žádné parcelní záznamy.")
    
    return df

# ==============================================================================
# Hlavní spuštění
# ==============================================================================
if __name__ == "__main__":
    # Zadání vstupních údajů
    kat_uzemi = "Malešice"   # Název katastrálního území
    parc_cislo = "875"      # Parcelní číslo
    
    # Získání dat o parcele a vytvoření DataFrame
    df_parcel = get_parcel_data(kat_uzemi, parc_cislo)
    print(df_parcel)


    # Uložení DataFrame do CSV pro pozdější import do databáze
    #csv_filename = "parcel_data.csv"
    #df_parcel.to_csv(csv_filename, index=False)
    #print(f"\nData byla uložena do souboru '{os.path.abspath(csv_filename)}'.")


In [ ]:
# Testovani API CUZK pro parcely

import requests
import json

API_KEY = "2aB6dTFdcNhLosNIiHEwyhBXt8k26V"     # váš klíč, čistě ASCII
HEADERS = {"ApiKey": API_KEY, "Accept": "application/json"}

params = {
    "kmenoveCisloParcely":   2460,    # část před lomítkem
    "druhCislovaniParcely":   2,      # 1 = stavební, 2 = parcelní
    "poddeleniCislaParcely": 70,      # část za lomítkem
    "typParcely":           "PKN",    # PKN = pozemek, PZE = právo zástavní
    "kodKatastralnihoUzemi":762733    # kód KÚ
}

r = requests.get(
    "https://api-kn.cuzk.gov.cz/api/v1/Parcely/Vyhledani",
    headers=HEADERS,
    params=params
)
r.raise_for_status()
parcel = r.json()["data"][0]

# Strukturovaný výpis
print("\n=== Základní údaje o parcele ===")
print(f"ID parcely:              {parcel['id']}")
print(f"Typ parcely:             {parcel['typParcely']}")
print(f"Kód KÚ:                  {parcel['katastralniUzemi']['kod']} — {parcel['katastralniUzemi']['nazev']}")
print(f"Parcelní číslo:          {parcel['kmenoveCisloParcely']}/{parcel['poddeleniCislaParcely']}")
print(f"Výměra (m²):             {parcel.get('vymera', '—')}")

print("\n=== LV (List vlastnictví) ===")
lv = parcel.get("lv", {})
print(f"  LV ID:                 {lv.get('id', '—')}")
print(f"  Číslo listu vlast.:    {lv.get('cislo', '—')}")
print(f"  KÚ LV:                 {lv.get('katastralniUzemi', {}).get('kod', '—')}")

print("\n=== BPEJ (půdní druhy) ===")
for b in parcel.get("bpej", []):
    print(f"  • Kód: {b.get('kod')}  Výmera: {b.get('vymera')} m²")

print("\n=== Řízení / plomby ===")
for rizo in parcel.get("rizeniPlomby", []):
    print(f"  • ID řízení: {rizo.get('id')}, typ: {rizo.get('typRizeni')}, rok: {rizo.get('rok')}, Číslo: {rizo.get('poradoveCislo')}")

# Pokud byste chtěli vidět celý záznam v pěkném JSON formátu:
print("\n=== Suplný JSON záznam ===")
print(json.dumps(parcel, ensure_ascii=False, indent=2))




In [ ]:
# Testování tahání info z KN podle ID pacely
import requests

API_KEY = "2aB6dTFdcNhLosNIiHEwyhBXt8k26V"   
HEADERS = {"ApiKey": API_KEY, "Accept": "application/json"}

# 1) Přímo podle ID
parc_id = 93678394010
r = requests.get(
    f"https://api-kn.cuzk.gov.cz/api/v1/Parcely/{parc_id}",
    headers=HEADERS
)
r.raise_for_status()
detail = r.json().get("data")    # nebo r.json()["data"]
print(detail)


In [1]:
# *** 1 *** DOPLŇOVÁNÍ INFORMACÍ Z KATASTRU NEMOVITOSTÍ POMOCÍ SLUŽBY WFS K ****POZEMKŮM + POZEMKŮM PRO BYTY + POZEMKY K BUDOVAM **** STACI POUSTET TOTO   FUNKČNÍ****
#/////////////////////////////////////////////////////////////////////////////////////////
# VSTUPNÍ DATA = Valuo_data
# výstupní data v KN_parcel_data
# Melo by to fungovat i pro pozemky
#
#/////////////////////////////////////////////////////////////////////////////////////////



import requests
from lxml import etree
from pyproj import Transformer
import pandas as pd
import os
import urllib.parse
import logging
import re  # Import regulárních výrazů
from sqlalchemy import create_engine, text


# ==============================================================================
# Nastavení logování: výpis na konzoli i do souboru "process_log.txt"
# ==============================================================================
logger = logging.getLogger("ParcelProcessing")
logger.setLevel(logging.DEBUG)
formatter = logging.Formatter('%(asctime)s - %(levelname)s - %(message)s')

# Handler pro konzoli
console_handler = logging.StreamHandler()
console_handler.setLevel(logging.INFO)
console_handler.setFormatter(formatter)
logger.addHandler(console_handler)

# Handler pro soubor
file_handler = logging.FileHandler("process_log.txt", encoding="utf-8")
file_handler.setLevel(logging.DEBUG)
file_handler.setFormatter(formatter)
logger.addHandler(file_handler)

# ==============================================================================
# Nova Funkce pro parsování ku a parc.c. pro budovy
# ==============================================================================

def extract_parcels_budovy(popis, default_kat_uzemi=None):
    import re
    results = []
    last_kat = default_kat_uzemi

    # Kontextová detekce stavební parcely
    is_stavebni = bool(re.search(r"\bstavební\b|\bstavba\b|\bč\.\s*\d+", popis, flags=re.IGNORECASE))

    parcel_matches = re.finditer(
        r"\b(?:st\.\s*)?\d+(?:/\d+)?(?:\s+[A-ZÁ-Ža-ž0-9\- ]+)?",
        popis
    )

    ignore_keywords = ["č.p.", "č.e.", "č.p", "č.e", "č.", "č", "čst", "stavba", "součástí"]

    for match in parcel_matches:
        segment = match.group(0).strip()

        # Odfiltruj výskyty č.p./č.e. atp.
        if any(kw in popis.lower()[match.start()-15:match.end()+15].lower() for kw in ignore_keywords):
            continue

        seg_match = re.match(r"(?i)^(st\.\s*)?(\d+(?:/\d+)?)(?:\s+(.+))?$", segment)
        if seg_match:
            prefix = seg_match.group(1) or ""
            parc_number = seg_match.group(2)
            kat = seg_match.group(3).strip() if seg_match.group(3) else None

            # Přidej prefix `st.` pokud:
            # - buď byl uveden
            # - nebo byl rozpoznán stavební kontext
            if prefix or is_stavebni:
                prefix = "st. "

            parc_cislo = f"{prefix}{parc_number}".strip()
            kat = kat if kat else last_kat
            last_kat = kat

            results.append((kat, parc_cislo))

    return results




# ==============================================================================
# Funkce pro parsování adresy podle adresa a popis (původní logika)
# ==============================================================================
def parse_address(adresa, popis):
    """
    Vrátí tuple (kat_uzemi, parc_cislo) na základě informací ve sloupci 'adresa'.
    
    Použije se primárně hodnota ze sloupce adresa (očekává se formát "<kat_uzemi> <parcelní číslo>").
    Pokud zároveň sloupec 'popis' obsahuje slovo "stavební" (case-insensitive),
    potom se parcelní číslo upraví tak, že pokud nezačíná "st. " (s mezerou za tečkou), přidá se předpona "st. ".
    
    Příklad:
      adresa = "Dolní Břežany 273"
      popis  = "stavební č. 273 Dolní Břežany (součástí je stavba rozestav. budova)"
      Vrátí: ("Dolní Břežany", "st. 273")
    """
    try:
        kat_uzemi, parc_cislo = adresa.rsplit(" ", 1)
    except ValueError:
        raise ValueError(f"Adresa '{adresa}' nemá očekávaný formát.")
    
    if popis and "stavební" in popis.lower():
        # Pokud parcelní číslo již nezačíná s "st. ", přidáme předponu "st. " s mezerou
        if not parc_cislo.lower().startswith("st. "):
            parc_cislo = "st. " + parc_cislo
    return kat_uzemi, parc_cislo

# ==============================================================================
# Nová funkce pro extrakci parcelních čísel a katastrálních území z pole "popis"
# ==============================================================================
def extract_parcels_from_popis(popis, default_kat_uzemi=None):
    """
    Extrahuje seznam dvojic (kat_uzemi, parc_cislo) z textu v poli 'popis'.
    
    Vyhledá část textu za výrazem "na parcele" až do výskytu klíčových slov ("podíl" nebo "(součástí")
    nebo do konce řetězce, pokud klíčová slova chybí.
    
    Následně rozdělí text podle čárek a pro každý segment pomocí regulárního výrazu extrahuje:
      - volitelný prefix "st. ",
      - parcelní číslo (čísla, případně s lomítkem a dalšími čísly),
      - název katastrálního území (pokud není uvedeno, použije se předchozí hodnota nebo default_kat_uzemi).
      
    Pokud byl prefix "st. " nalezen, výsledné parcelní číslo bude obsahovat tento prefix.
    """
    import re
    # Rozšířený regex: zachytí text za "na parcele" až do výskytu "podíl", "(součástí" nebo konce řetězce.
    match = re.search(r"na parcele\s+(.+?)(?=\s*(podíl|\(součástí)|$)", popis, re.IGNORECASE)
    if not match:
        return []
    
    # Odebere případné koncové čárky a nepotřebné mezery
    parcel_section = match.group(1).strip().rstrip(",")
    segments = [seg.strip() for seg in parcel_section.split(",") if seg.strip()]
    
    results = []
    last_kat = default_kat_uzemi  # počáteční hodnota katastrálního území
    
    for seg in segments:
        # Regex: volitelný prefix "st. ", číslo (možno s lomítkem) a volitelný název katastrálního území
        seg_match = re.match(r"(?i)^(st\.\s*)?(\d+(?:/\d+)?)(?:\s+(.+))?$", seg)
        if seg_match:
            prefix = seg_match.group(1) or ""
            parc_number = seg_match.group(2)
            # Ujistíme se, že pokud je prefix přítomen, má formu "st. " (s mezerou)
            if prefix and not prefix.lower().startswith("st. "):
                prefix = "st. "
            parc_cislo = f"{prefix}{parc_number}".strip()
            
            # Pokud je uveden název katastrálního území, použijeme jej a aktualizujeme last_kat.
            # Jinak použijeme poslední známou hodnotu (nebo default).
            kat = seg_match.group(3).strip() if seg_match.group(3) else None
            if kat:
                last_kat = kat
            else:
                kat = last_kat
            
            results.append((kat, parc_cislo))
    
    return results



# ==============================================================================
# Funkce pro získání kódu katastrálního území (UPPER_ZONING_ID) podle názvu ku a okresu
# ==============================================================================

# Globální cache slovník (klíč = (zoning_name, okres))
zoning_code_cache = {}

def get_zoning_code(zoning_name, okres=None):
    """
    Vrátí kód katastrálního území (upper_zoning_id) podle názvu a případně okresu.
    Výsledky jsou cacheovány pro urychlení opakovaných dotazů.
    """
    import requests
    from lxml import etree

    key = (zoning_name.lower(), okres.lower() if okres else None)
    if key in zoning_code_cache:
        logger.info(f"Získáno z cache: {key} → {zoning_code_cache[key]}")
        return zoning_code_cache[key]

    base_url = "https://services.cuzk.cz/wfs/inspire-CP-wfs.asp?"
    params = {
        "service": "WFS",
        "version": "2.0.0",
        "request": "GetFeature",
        "storedQuery_id": "GetZoningByName",
        "ZONING_NAME": zoning_name
    }

    logger.info(f"Dotaz na kód KU: '{zoning_name}'" + (f", okres: '{okres}'" if okres else ""))
    response = requests.get(base_url, params=params)
    logger.debug(f"HTTP status (GetZoningByName): {response.status_code}")

    if response.status_code != 200:
        logger.warning(f"Nepodařilo se získat data pro '{zoning_name}' (HTTP {response.status_code})")
        zoning_code_cache[key] = None
        return None

    try:
        tree = etree.fromstring(response.content)
    except Exception as e:
        logger.error(f"Chyba při parsování XML (GetZoningByName): {e}")
        zoning_code_cache[key] = None
        return None

    ns = {
        "CP": "http://inspire.ec.europa.eu/schemas/cp/4.0",
        "base": "http://inspire.ec.europa.eu/schemas/base/3.3",
        "wfs": "http://www.opengis.net/wfs/2.0"
    }

    zoning_elements = tree.findall(".//CP:CadastralZoning", namespaces=ns)
    if not zoning_elements:
        logger.warning(f"Žádné záznamy pro '{zoning_name}' nenalezeny.")
        zoning_code_cache[key] = None
        return None

    selected_code = None
    fallback_code = None

    for elem in zoning_elements:
        admin_elem = elem.find("CP:administrativeUnit", namespaces=ns)
        okres_name = admin_elem.get("{http://www.w3.org/1999/xlink}title") if admin_elem is not None else ""

        zoning_id_elem = elem.find("CP:inspireId/base:Identifier/base:localId", namespaces=ns)
        if zoning_id_elem is None or not zoning_id_elem.text:
            continue

        zoning_id_full = zoning_id_elem.text.strip()
        zoning_id = zoning_id_full[3:] if zoning_id_full.startswith("CZ.") else zoning_id_full

        if not fallback_code:
            fallback_code = zoning_id

        if okres and okres.lower() in okres_name.lower():
            logger.info(f"Nalezen kód KU (shoda s okresem '{okres}'): {zoning_id} (okres: {okres_name})")
            zoning_code_cache[key] = zoning_id
            return zoning_id

    if fallback_code:
        logger.warning(f"Nebyla nalezena shoda s okresem '{okres}', použita fallback hodnota: {fallback_code}")
        zoning_code_cache[key] = fallback_code
        return fallback_code

    logger.warning("Nebyl nalezen žádný platný kód KU.")
    zoning_code_cache[key] = None
    return None



def get_zoning_code_ku(zoning_name):    #  hleda pouze na zaklade názvu katastrálního území
    base_url = "https://services.cuzk.cz/wfs/inspire-CP-wfs.asp?"
    params = {
        "service": "WFS",
        "version": "2.0.0",
        "request": "GetFeature",
        "storedQuery_id": "GetZoningByName",
        "ZONING_NAME": zoning_name
    }
    logger.info(f"\nDotazuji katastrální území (GetZoningByName) pro: {zoning_name}")
    response = requests.get(base_url, params=params)
    logger.debug(f"HTTP status (GetZoningByName): {response.status_code}")
    
    filename = "zoning_response.xml"
    with open(filename, "wb") as f:
        f.write(response.content)
    logger.debug(f"XML odpověď (GetZoningByName) uložena: {os.path.abspath(filename)}")
    
    try:
        tree = etree.fromstring(response.content)
    except Exception as e:
        raise Exception(f"Chyba při parsování XML (GetZoningByName): {e}")
    
    ns = {
        "CP": "http://inspire.ec.europa.eu/schemas/cp/4.0",
        "base": "http://inspire.ec.europa.eu/schemas/base/3.3",
        "wfs": "http://www.opengis.net/wfs/2.0"
    }
    zoning_id_elem = tree.find(".//CP:CadastralZoning/CP:inspireId/base:Identifier/base:localId", namespaces=ns)
    if zoning_id_elem is not None and zoning_id_elem.text:
        zoning_id_full = zoning_id_elem.text.strip()
        logger.info(f"Nalezený identifikátor (full): {zoning_id_full}")
        zoning_id = zoning_id_full[3:] if zoning_id_full.startswith("CZ.") else zoning_id_full
        logger.info(f"Vyhodnocený kód katastrálního území (UPPER_ZONING_ID): {zoning_id}")
        return zoning_id
    else:
        logger.info("Nebyl nalezen identifikátor katastrálního území.")
        return None

# ==============================================================================
# Funkce pro získání dat o parcele a vytvoření DataFrame pro jeden záznam
# ==============================================================================
def get_parcel_data(zoning_name, parcel_number):
    """
    Na základě názvu katastrálního území a parcelního čísla získá podrobné informace o parcele
    prostřednictvím uloženého dotazu GetParcel a vrátí DataFrame s extrahovanými daty.
    Pokud nejsou nalezeny žádné záznamy, diagnostikuje možné důvody a vrátí prázdný DataFrame.
    """
    upper_zoning_id = get_zoning_code(zoning_name=row["kat_uzemi"], okres=row["okres"])
    if not upper_zoning_id:
        raise Exception("Nepodařilo se získat kód katastrálního území.")
    
    base_url = "https://services.cuzk.cz/wfs/inspire-CP-wfs.asp?"
    params = {
        "service": "WFS",
        "version": "2.0.0",
        "request": "GetFeature",
        "storedQuery_id": "GetParcel",
        "UPPER_ZONING_ID": upper_zoning_id,
        "TEXT": parcel_number
    }
    
    logger.info("\nSestavuji dotaz pomocí storedQuery 'GetParcel'...")
    logger.info(f"Základní URL: {base_url}")
    for k, v in params.items():
        logger.info(f"  {k}: {v}")
    
    response = requests.get(base_url, params=params)
    logger.info(f"HTTP status kód odpovědi (GetParcel): {response.status_code}")
    
    filename = "parcel_response.xml"
    with open(filename, "wb") as f:
        f.write(response.content)
    logger.info(f"XML odpověď (GetParcel) uložena: {os.path.abspath(filename)}")
    
    try:
        tree = etree.fromstring(response.content)
    except Exception as e:
        raise Exception(f"Chyba při parsování XML (GetParcel): {e}")
    
    ns = {
        "wfs": "http://www.opengis.net/wfs/2.0",
        "gml": "http://www.opengis.net/gml/3.2",
        "CP": "http://inspire.ec.europa.eu/schemas/cp/4.0",
        "base": "http://inspire.ec.europa.eu/schemas/base/3.3"
    }
    
    members = tree.xpath("//wfs:member", namespaces=ns)
    logger.info(f"\nNalezeno {len(members)} feature (member) pro parcelu {parcel_number}.")
    
    records = []
    for mem in members:
        parcel_elem = mem.find(".//CP:CadastralParcel", namespaces=ns)
        if parcel_elem is None:
            continue
        
        gml_id = parcel_elem.get("{http://www.opengis.net/gml/3.2}id")
        
        area_elem = parcel_elem.find("CP:areaValue", namespaces=ns)
        try:
            area_val = float(area_elem.text.strip()) if area_elem is not None and area_elem.text else None
        except ValueError:
            area_val = None
        
        begin_elem = parcel_elem.find("CP:beginLifespanVersion", namespaces=ns)
        begin_val = begin_elem.text.strip() if begin_elem is not None and begin_elem.text else None
        
        end_elem = parcel_elem.find("CP:endLifespanVersion", namespaces=ns)
        end_val = end_elem.text.strip() if (end_elem is not None and end_elem.text) else None
        
        geom_elem = parcel_elem.find("CP:geometry/gml:Polygon/gml:exterior/gml:LinearRing/gml:posList", namespaces=ns)
        geometry_text = geom_elem.text.strip() if geom_elem is not None and geom_elem.text else None
        
        inspire_local = None
        inspire_namespace = None
        inspire_elem = parcel_elem.find("CP:inspireId/base:Identifier", namespaces=ns)
        if inspire_elem is not None:
            local_elem = inspire_elem.find("base:localId", namespaces=ns)
            ns_elem = inspire_elem.find("base:namespace", namespaces=ns)
            inspire_local = local_elem.text.strip() if local_elem is not None and local_elem.text else None
            inspire_namespace = ns_elem.text.strip() if ns_elem is not None and ns_elem.text else None
        
        label_elem = parcel_elem.find("CP:label", namespaces=ns)
        label_val = label_elem.text.strip() if label_elem is not None and label_elem.text else None
        
        ref_elem = parcel_elem.find("CP:nationalCadastralReference", namespaces=ns)
        ref_val = ref_elem.text.strip() if ref_elem is not None and ref_elem.text else None
        
        ref_point_elem = parcel_elem.find("CP:referencePoint/gml:Point/gml:pos", namespaces=ns)
        if ref_point_elem is not None and ref_point_elem.text:
            coords = ref_point_elem.text.strip().split()
            if len(coords) >= 2:
                try:
                    x = float(coords[0])
                    y = float(coords[1])
                except ValueError:
                    x, y = None, None
            else:
                x, y = None, None
        else:
            x, y = None, None
        
        valid_from_elem = parcel_elem.find("CP:validFrom", namespaces=ns)
        valid_from_val = valid_from_elem.text.strip() if valid_from_elem is not None and valid_from_elem.text else None
        
        admin_elem = parcel_elem.find("CP:administrativeUnit", namespaces=ns)
        admin_href = admin_elem.get("{http://www.w3.org/1999/xlink}href") if admin_elem is not None else None
        admin_title = admin_elem.get("{http://www.w3.org/1999/xlink}title") if admin_elem is not None else None
        
        zoning_elem = parcel_elem.find("CP:zoning", namespaces=ns)
        zoning_href = zoning_elem.get("{http://www.w3.org/1999/xlink}href") if zoning_elem is not None else None
        zoning_title = zoning_elem.get("{http://www.w3.org/1999/xlink}title") if zoning_elem is not None else None
        
        if x is not None and y is not None:
            transformer = Transformer.from_crs("EPSG:5514", "EPSG:4326", always_xy=True)
            lon, lat = transformer.transform(x, y)
        else:
            lon, lat = None, None
        
        record = {
            "kat_uzemi": zoning_name,
            "upper_zoning_id": upper_zoning_id,
            "parcel_number": parcel_number,
            "gml_id": gml_id,
            "areaValue_m2": area_val,
            "beginLifespanVersion": begin_val,
            "endLifespanVersion": end_val,
            "geometry": geometry_text,
            "inspire_localId": inspire_local,
            "inspire_namespace": inspire_namespace,
            "label": label_val,
            "nationalCadastralReference": ref_val,
            "refPoint_x": x,
            "refPoint_y": y,
            "refPoint_lon": lon,
            "refPoint_lat": lat,
            "validFrom": valid_from_val,
            "administrativeUnit_href": admin_href,
            "administrativeUnit_title": admin_title,
            "zoning_href": zoning_href,
            "zoning_title": zoning_title
        }
        records.append(record)
    
    if records:
        df = pd.DataFrame(records)
        logger.info("\nDataFrame s informacemi o parcele:")
        logger.info(df)
    else:
        fc = tree.xpath("/wfs:FeatureCollection", namespaces={"wfs": "http://www.opengis.net/wfs/2.0"})
        if fc:
            fc_elem = fc[0]
            num_matched = fc_elem.get("numberMatched", "není uvedeno")
            num_returned = fc_elem.get("numberReturned", "není uvedeno")
            logger.info("\nFeatureCollection:")
            logger.info(f"  numberMatched = {num_matched}")
            logger.info(f"  numberReturned = {num_returned}")
        xml_preview = response.text[:500]
        logger.info("\nNáhled raw XML odpovědi:")
        logger.info(xml_preview)
        logger.info("\nMožné důvody nenalezení parcely:")
        logger.info("  1. Zadané katastrální území nebo parcelní číslo neodpovídá formátu dat v systému.")
        logger.info("  2. Daná parcela se v databázi nenachází (mimo digitální mapu).")
        logger.info("  3. Chyba ve filtru nebo nesprávné rozdělení vstupního řetězce.")
        df = pd.DataFrame()  # prázdný DataFrame
    return df

# ==============================================================================
# Hlavní spuštění: Načtení vstupních dat z DB, zpracování parcel, vložení do DB a souhrnné statistiky
# ==============================================================================
if __name__ == "__main__":
    from sqlalchemy import create_engine
    import urllib.parse
    
    # Připojení k DB Valuo pomocí SQLAlchemy
    params_conn = urllib.parse.quote_plus(
        "Driver={ODBC Driver 17 for SQL Server};"
        "Server=localhost;"
        "Database=VALUO;"
        "Trusted_Connection=yes;"
    )
    connection_url = f"mssql+pyodbc:///?odbc_connect={params_conn}"
    engine = create_engine(connection_url)
    
    # Načtení vstupních dat z tabulky Valuo_data, kde nemovitost = 'byt'
    query = """
	SELECT id AS id_valuo, okres, kat_uzemi, adresa, popis
    FROM Valuo_data 
    WHERE 1=1
         --AND kat_uzemi = 'Krč'
         --AND typ = 'byt'
         --AND nemovitost = 'parcela'
         --AND id in (47687)
         AND KN_WFS_info IS NULL;
         --AND KN_WFS_info = 0;
    """
    df_input = pd.read_sql(query, engine)
    logger.info("\nVstupní data z DB:")
    logger.info(df_input.head())
    
    total_db_records = len(df_input)
    queries_attempted = 0
    successful_queries = 0
    unsuccessful_ids = []  # seznam id_valuo, pro které dotaz nenašel parcelu
    
    df_list = []
    
for idx, row in df_input.iterrows():
    id_valuo = row["id_valuo"]
    adresa = row["adresa"].strip()
    popis = row["popis"].strip() if row["popis"] is not None else ""
    
    if not adresa:
        continue

    # ========================
    # 1) Nová logika s 'popis'
    # ========================
    parcels = []

    if "na parcele" in popis.lower():
        parcels = extract_parcels_from_popis(popis, default_kat_uzemi=row["kat_uzemi"])
    else:
        parcels = extract_parcels_budovy(popis, default_kat_uzemi=row["kat_uzemi"])
        
        if not parcels:
            try:
                kat_uzemi, parc_cislo = parse_address(adresa, popis)
                parcels = [(kat_uzemi, parc_cislo)]
            except Exception as e:
                logger.error(f"Chyba při fallback parsování adresy: {e}")
                unsuccessful_ids.append(id_valuo)
                continue

    # =============================
    # 2) Získání dat pro každou parcelu
    # =============================
    for (kat, parc) in parcels:
        queries_attempted += 1
        logger.info(f"\nZpracovávám záznam id_valuo={id_valuo}, adresa='{adresa}', parcelní info: {kat}, {parc}")
        try:
            df_parcel = get_parcel_data(kat, parc)
            if df_parcel is not None and not df_parcel.empty:
                successful_queries += 1
                df_parcel["id_valuo"] = id_valuo
                df_list.append(df_parcel)
            else:
                logger.info(f"Nebyly nalezeny data o parcele pro id_valuo={id_valuo} a parcelu {parc} ({kat}).")
                unsuccessful_ids.append(id_valuo)
        except Exception as e:
            logger.error(f"Chyba při zpracování id_valuo={id_valuo}, parcela {parc}: {e}")
            unsuccessful_ids.append(id_valuo)
        else:
            # Původní logika pro případy, kdy se nejedná o nové zdrojové údaje
            try:
                if popis and "stavební" in popis.lower():
                    kat_uzemi, parc_cislo = parse_address(adresa, popis)
                else:
                    kat_uzemi, parc_cislo = parse_address(adresa, "")
                queries_attempted += 1
                logger.info(f"\nZpracovávám záznam id_valuo={id_valuo}, adresa='{adresa}'")
                df_parcel = get_parcel_data(kat_uzemi, parc_cislo)
                if df_parcel is not None and not df_parcel.empty:
                    successful_queries += 1
                    df_parcel["id_valuo"] = id_valuo
                    df_list.append(df_parcel)
                else:
                    logger.info(f"Nebyly nalezeny data o parcele pro id_valuo={id_valuo}.")
                    unsuccessful_ids.append(id_valuo)
            except Exception as e:
                logger.error(f"Chyba při zpracování id_valuo={id_valuo}: {e}")
                unsuccessful_ids.append(id_valuo)
    
if df_list:
    df_all = pd.concat(df_list, ignore_index=True)
    logger.info("\nKonečný DataFrame se všemi získanými daty:")
    logger.info(df_all)
        
    # Vložení dat do tabulky KN_parcel_data
    df_all.to_sql("KN_parcel_data", con=engine, if_exists="append", index=False)
    inserted_rows = len(df_all)
    logger.info(f"\nData byla vložena do tabulky KN_parcel_data, počet vložených řádků: {inserted_rows}.")
else:
    df_all = pd.DataFrame()
    inserted_rows = 0 
    logger.info("Nebyla získána žádná data o parcelách.")
    
# Aktualizace tabulky Valuo_data:
# Pro záznamy, u kterých byly získány data, nastavíme KN_WFS_info = 1,
# a pro ty, kde nebyly data nalezeny, nastavíme KN_WFS_info = 0.
successful_ids = df_all["id_valuo"].unique().tolist() if not df_all.empty else []
# Předpokládáme, že všechny záznamy, které byly načteny z DB, jsou v df_input.
all_ids = df_input["id_valuo"].unique().tolist()
#all_ids = df_input["id_valuo"].iloc[:, 0].unique().tolist()
unsuccessful_ids = list(set(all_ids) - set(successful_ids))
    
# Aktualizace úspěšných záznamů: KN_WFS_info = 1
updated_success = 0
if successful_ids:
    id_str_success = ",".join(str(i) for i in successful_ids)
    update_query_success = f"UPDATE Valuo_data SET KN_WFS_info = 1 WHERE id IN ({id_str_success})"
    with engine.begin() as conn:
        result_success = conn.execute(text(update_query_success))
        updated_success = result_success.rowcount if result_success.rowcount is not None else len(successful_ids)
    logger.info(f"\nTabulka Valuo_data aktualizována: pro záznamy s id IN ({id_str_success}) bylo nastaveno KN_WFS_info = 1.")
    
# Aktualizace neúspěšných záznamů: KN_WFS_info = 0
updated_unsuccess = 0
if unsuccessful_ids:
    id_str_unsuccess = ",".join(str(i) for i in unsuccessful_ids)
    update_query_unsuccess = f"UPDATE Valuo_data SET KN_WFS_info = 0 WHERE id IN ({id_str_unsuccess})"
    with engine.begin() as conn:
        result_unsuccess = conn.execute(text(update_query_unsuccess))
        updated_unsuccess = result_unsuccess.rowcount if result_unsuccess.rowcount is not None else len(unsuccessful_ids)
    logger.info(f"\nTabulka Valuo_data aktualizována: pro záznamy s id IN ({id_str_unsuccess}) bylo nastaveno KN_WFS_info = 0.")
    
# Souhrnné statistiky
summary = "\n" + "="*30 + " SOUHRN STATISTIK " + "="*30 + "\n"
summary += f"Celkový počet načtených záznamů z DB Valuo_data: {len(all_ids)}\n"
summary += f"Počet dotazů odeslaných do katastru: {queries_attempted}\n"
summary += f"Počet úspěšně zodpovězených dotazů (parcely získány): {successful_queries}\n"
summary += f"Celkový počet nových řádků vložených do KN_parcel_data: {inserted_rows}\n"
summary += f"Počet aktualizovaných řádků v tabulce Valuo_data (KN_WFS_info=1): {updated_success}\n"
summary += f"Počet aktualizovaných řádků v tabulce Valuo_data (KN_WFS_info=0): {updated_unsuccess}\n"
summary += "="*80 + "\n"
logger.info(summary)
print(summary)


2026-10-01 13:09:50,539 - INFO - 
Vstupní data z DB:
2026-10-01 13:09:50,546 - INFO -    id_valuo               okres kat_uzemi  \
0    114107  Hlavní město Praha     Kamýk   
1    114108  Hlavní město Praha     Kamýk   
2    114109  Hlavní město Praha     Kamýk   
3    114110  Hlavní město Praha     Kamýk   
4    114111  Hlavní město Praha     Kamýk   

                                     adresa  \
0  Olbramovická 705/5, Kamýk, 14200 Praha 4   
1    Lojovická 847/47, Kamýk, 14200 Praha 4   
2                              Kamýk 1734/1   
3    Vnoučkova 516/12, Kamýk, 14200 Praha 4   
4     Imrychova 883/9, Kamýk, 14300 Praha 4   

                                               popis  
0  jednotka č. 7050018, byt v budově č.p. 704, 70...  
1  č. 1734/2 Kamýk (součástí je stavba č.p. 847, ...  
2                                    č. 1734/1 Kamýk  
3  jednotka č. 5160023, byt v budově č.p. 521, 51...  
4  jednotka č. 8830027, byt v budově č.p. 883, 88...  
2026-10-01 13:09:50,554 - INFO


============================== SOUHRN STATISTIK ==============================
Celkový počet načtených záznamů z DB Valuo_data: 2856
Počet dotazů odeslaných do katastru: 7648
Počet úspěšně zodpovězených dotazů (parcely získány): 4119
Celkový počet nových řádků vložených do KN_parcel_data: 4119
Počet aktualizovaných řádků v tabulce Valuo_data (KN_WFS_info=1): 2609
Počet aktualizovaných řádků v tabulce Valuo_data (KN_WFS_info=0): 247



In [2]:
#  *** 2 *** SQL query pro tahani PARCEL a BYTU k vizualizaci
query_pozemky = """
WITH 
-- 1) Základní CTE: vybereme jen ty záznamy, kde 
--    a) všechny řádky se stejným cislo_vkladu jsou typu 'parcela'
--    b) žádný záznam nemá GPS_API_info = 'ERR'
ValidValuo AS (
    SELECT *
    FROM dbo.Valuo_data
    WHERE cislo_vkladu IN (
        SELECT cislo_vkladu
        FROM dbo.Valuo_data
        GROUP BY cislo_vkladu
        HAVING 
            COUNT(*) = COUNT(CASE WHEN nemovitost = 'parcela' THEN 1 END)
            AND COUNT(CASE WHEN GPS_API_info = 'ERR' THEN 1 END) = 0
    )
),

-- 2) CTE pro spočtení počtu DISTINCT adres (počet parcel) pro každý cislo_vkladu
ParcelCounts AS (
    SELECT 
        V.cislo_vkladu,
        COUNT(DISTINCT V.adresa) AS ParcelCount
    FROM dbo.Valuo_data AS V
    LEFT JOIN dbo.KN_parcel_data AS K
        ON K.id_valuo = V.id
    GROUP BY V.cislo_vkladu
),

-- 3) Nové CTE: z ValidValuo vezmeme všechna pole a navíc spočítáme 
--    celkovou plochu (SUM_PLOCHA) pro každý cislo_vkladu pomocí window-funkce
ValuoWithSum AS (
    SELECT
        V.*,
        SUM(V.plocha) OVER (PARTITION BY V.cislo_vkladu) AS SUM_PLOCHA
    FROM ValidValuo AS V
)

-- 4) Hlavní SELECT: 
SELECT
    VWS.*,
    K.upper_zoning_id,
    K.parcel_number,
    K.gml_id,
    K.areaValue_m2,
    K.beginLifespanVersion,
    K.endLifespanVersion,
    K.geometry,
    K.inspire_localId,
    K.inspire_namespace,
    K.label,
    K.nationalCadastralReference,
    K.refPoint_x,
    K.refPoint_y,
    K.refPoint_lon,
    K.refPoint_lat,
    K.validFrom,
    K.administrativeUnit_href,
    K.administrativeUnit_title,
    K.zoning_href,
    K.zoning_title,
    K.id_valuo,
    -- Jednotková cena (JC) za metr čtvereční: cenovy_udaj / SUM_PLOCHA, zaokrouhleno a přetypováno na DECIMAL(38,0)
    CAST(
        ROUND(
            VWS.cenovy_udaj 
            / NULLIF(VWS.SUM_PLOCHA, 0), 
            0
        ) 
        AS DECIMAL(38,0)
    ) AS JC,
    -- Počet parcel pro dané cislo_vkladu z předchozího CTE
    PC.ParcelCount AS [#PARCEL],
    -- Celková plocha všech parcel v řízení jako samostatný sloupec
    VWS.SUM_PLOCHA AS SUM_PARCEL_RIZENI,
    -- Nově přidané sloupce z tabulky UP_FVU_data
    U.KODFP1_A,
    U.ZAS1,
    U.CSO1,
    U.KODFP2_A,
    U.ZAS2,
    U.CSO2,
    U.POPIS_Z
FROM ValuoWithSum AS VWS
LEFT JOIN dbo.KN_parcel_data AS K
    ON K.id_valuo = VWS.id
-- Připojení tabulky UP_FVU_data
LEFT JOIN dbo.UP_FVU_data AS U
    ON U.id = K.id_UP_FVU_data
LEFT JOIN ParcelCounts AS PC
    ON PC.cislo_vkladu = VWS.cislo_vkladu
WHERE 
    1 = 1
    -- Dále filtrujeme tak, aby jednotková cena (JC) byla > 0:
    AND 
    CAST(
        ROUND(
            VWS.cenovy_udaj 
            / NULLIF(VWS.SUM_PLOCHA, 0), 
            0
        ) 
        AS DECIMAL(38,0)
    ) > 0
    -- A zároveň aby kat_uzemi bylo v požadovaném seznamu
    -- AND VWS.kat_uzemi IN ('Písnice', 'Kunratice', 'Libuš');
    -- Pokud chcete vyzkoušet jiný filtr na katastr:
    -- AND VWS.kat_uzemi IN ('Škvorec')

    -- Pro konkrétní cislo_vkladu (jen jeden příklad):
    -- AND VWS.cislo_vkladu = 'V-10027/2023-211';
	AND KN_WFS_info = 1
;



    """



query_byty = """
WITH 
-- 1) CTE: vybereme jen ty záznamy, kde 
--    a) má každé cislo_vkladu právě jeden řádek
--    b) tento řádek má typ = 'byt'
ValidValuo AS (
    SELECT *
    FROM dbo.Valuo_data
    WHERE cislo_vkladu IN (
        SELECT cislo_vkladu
        FROM dbo.Valuo_data
        GROUP BY cislo_vkladu
        HAVING 
            COUNT(*) = 1
            AND MAX(typ) = 'byt'
    )
),

-- 2) CTE: aplikujeme základní filtry (plocha ≠ 0, cenovy_udaj ≠ 0) 
--    + spočteme jednotkovou cenu (JC) pro každý řádek 
--    + připojíme data z KN_parcel_data a UP_FVU_data
JC_filtr AS (
    SELECT 
        V.*,  -- Všechny původní sloupce z ValidValuo
        -- Sloupce z KN_parcel_data, bez konfliktu názvů
        K.upper_zoning_id,
        K.parcel_number,
        K.gml_id,
        K.areaValue_m2,
        K.beginLifespanVersion,
        K.endLifespanVersion,
        K.geometry,
        K.inspire_localId,
        K.inspire_namespace,
        K.label,
        K.nationalCadastralReference,
        K.refPoint_x,
        K.refPoint_y,
        K.refPoint_lon,
        K.refPoint_lat,
        K.validFrom,
        K.administrativeUnit_href,
        K.administrativeUnit_title,
        K.zoning_href,
        K.zoning_title,
        K.id_valuo,
        K.kat_uzemi AS kn_kat_uzemi,  -- přejmenování, aby nekolidovalo s V.kat_uzemi
        -- Výpočet jednotkové ceny JC: cenovy_udaj / SUM(plocha) OVER (PARTITION BY cislo_vkladu)
/*        CAST(
            ROUND(
                V.cenovy_udaj 
                / NULLIF(SUM(V.plocha) OVER (PARTITION BY V.cislo_vkladu), 0), 
                0
            ) 
            AS DECIMAL(38,0)
        ) AS JC,
*/

		CAST(ROUND((V.cenovy_udaj / V.plocha),0) AS DECIMAL(38,0)) as JC,
        -- Nově přidáno: sloupce z UP_FVU_data
        U.KODFP1_A,
        U.ZAS1,
        U.CSO1,
        U.KODFP2_A,
        U.ZAS2,
        U.CSO2,
        U.POPIS_Z
    FROM ValidValuo AS V
    LEFT JOIN dbo.KN_parcel_data AS K 
        ON K.id_valuo = V.id
    -- Připojení tabulky UP_FVU_data přes cizí klíč v KN_parcel_data
    LEFT JOIN dbo.UP_FVU_data AS U
        ON U.id = K.id_UP_FVU_data
    WHERE 
        V.plocha <> 0
        AND V.cenovy_udaj <> 0
        -- Zde lze případně přidat další filtry, např. podle katastru:
        -- AND V.kat_uzemi = 'Škvorec'
		-- AND cislo_vkladu = 'V-46702/2024-101'
)

-- 3) Výběr finálních řádků z CTE JC_filtr
SELECT *
FROM JC_filtr
-- Možnost dodatečného filtru na JC:
-- WHERE JC >= 69600;
;



"""

In [3]:
# *** 3 *** SPOJENÍ MAPOVÝCH PODKLADŮ - VALUO + KATASTR + ÚZEMNÍ PLÁN PRAHY ******************** VRSTVY - POZEMKY, BYTY ********* UPRAVA POPUPU + GRAFY****** FUNKCN


import pandas as pd
import geopandas as gpd
from shapely.geometry import Polygon

import folium
from folium import Map
from folium.elements import MacroElement
from folium.raster_layers import WmsTileLayer

from typing import Union

import logging
import urllib.parse
from sqlalchemy import create_engine

from jinja2 import Template
import webbrowser

from shapely.geometry import Polygon
from shapely.errors import TopologicalError

import io
import base64
import matplotlib.pyplot as plt

# ==============================================================================
# 1) Logging
# ==============================================================================
logger = logging.getLogger("ParcelViz")
logger.setLevel(logging.DEBUG)
fmt = logging.Formatter('%(asctime)s - %(levelname)s - %(message)s')
ch = logging.StreamHandler();   ch.setLevel(logging.INFO);  ch.setFormatter(fmt);  logger.addHandler(ch)
fh = logging.FileHandler("process_log.txt", encoding="utf-8"); fh.setLevel(logging.DEBUG); fh.setFormatter(fmt); logger.addHandler(fh)

# ==============================================================================
# 2) Konstanty
# ==============================================================================
EXCHANGE_RATE_EUR_CZK = 25.0

# ==============================================================================
# 3) Pomocné funkce
# ==============================================================================

""" def parse_geometry(geom_str):
    try:
        coords = list(map(float, geom_str.split()))
        return Polygon([(coords[i], coords[i+1]) for i in range(0, len(coords), 2)])
    except Exception as e:
        logger.error(f"Chyba při převodu geometrie: {e}")
        return None """

def parse_geometry(geom_str):
    """
    Parsuje řetězec souřadnic na shapely.geometry.Polygon.
    - Pokud je vstup None/NaN nebo se objeví jakákoliv chyba,
      zaloguje ji a vrátí None.
    """
    # pokud je geom_str None (nebo v pandas NaN), rovnou skončíme
    if geom_str is None:
        logger.debug("Empty geometry string, returning None")
        return None

    try:
        coords = list(map(float, geom_str.split()))
        poly = Polygon([(coords[i], coords[i+1]) 
                        for i in range(0, len(coords), 2)])
        return poly

    except ValueError as e:
        logger.error(f"Non-numeric coordinate in geometry '{geom_str}': {e}")
        return None

    except IndexError as e:
        logger.error(
            f"Odd number of coordinate values in '{geom_str}', "
            "expected pairs of (x, y)."
        )
        return None

    except TopologicalError as e:
        logger.error(f"Invalid polygon topology for '{geom_str}': {e}")
        return None

    except Exception as e:
        # poslední pojistka pro neočekávané chyby
        logger.error(f"Chyba při převodu geometrie '{geom_str}': {e}")
        return None

#def format_thousand_space(val):
#    try:
#        return f"{float(val):,.0f}".replace(",", " ")
#    except:
#        return str(val)

def format_datum_podani(datum_str):
    """
    Převede datum 'YYYY-MM-DD HH:MM:SS.sss' na formát:
    MĚSÍC/ROK, (původní celý datum/časový údaj).
    Např. '2024-12-02 13:17:27.000' -> '<strong>12/2024</strong>, (2024-12-02 13:17:27.000)'
    Pokud parsování selže, vrátí původní řetězec.
    """
    try:
        dt_parsed = pd.to_datetime(datum_str)
        month_year = dt_parsed.strftime("%m/%Y")
        return f"<strong>{month_year}</strong>, ({datum_str})"
    except:
        return datum_str


def format_thousand_space(val, decimals: int = 2) -> str:
    """
    Formátuje číslo s mezerami jako oddělovači tisíců
    a čárkou jako desetinou čárkou.

    - Pro celočíselné hodnoty (např. 10560.0) vrátí "10 560"
    - Pro hodnoty s desetinnou částí (např. 56.39) vrátí "56,39"
      (vždy s přesně `decimals` místy za čárkou)
    """
    try:
        fval = float(val)
    except (ValueError, TypeError):
        # pokud se to nepovede převést na float, vrať původní řetězec
        return str(val)

    # celočíselné
    if fval.is_integer():
        # int(fval) odstraní .0 a f"{:,}" vloží čárky pro tisíce
        s = f"{int(fval):,}"
        # čárky jako tisícové oddělovače zaměníme za mezery
        return s.replace(",", " ")

    # má desetinnou část → formátujeme s pevnými `decimals` místy
    # f"{fval:,.2f}" => "1,234.56" nebo "56.39"
    s = f"{fval:,.{decimals}f}"
    # čárky pro tisíce → mezery, tečku desetinnou → čárka
    return s.replace(",", " ").replace(".", ",")


# ========================================================================
# Upravená funkce pro pozemky 
# ========================================================================
def aggregate_popup_pozemky(g):
    """
    Vytvoří HTML pro popup u POZEMKŮ:
    - seřadí řízení sestupně podle datum_podání,
    - vykreslí scrollovatelný blok s informacemi,
    - pokud je více než jedno řízení, doplní pod něj malý graf datum vs. JC,
    - dole vypíše průměrnou JC, počet řízení a odkaz na katastr.
    """
    import io, base64
    import matplotlib.pyplot as plt
    import numpy as np
    import matplotlib.dates as mdates

    first = g.iloc[0]
    entries = []
    jc_values = []
    computed = []

    # 1) Sestavíme seznam (cislo_vkladu, datum_podani, JC, subdf)
    for cislo, subdf in g.groupby('cislo_vkladu'):
        row = subdf.iloc[0]
        datum_raw = pd.to_datetime(row['datum_podani'])
        jc_val = float(row.get('JC') or 0)
        if row.get('mena') == 'EUR':
            jc_val *= EXCHANGE_RATE_EUR_CZK
        jc_values.append(jc_val)
        computed.append((cislo, datum_raw, jc_val, subdf))

    # 2) Seřadíme sestupně podle data podání
    computed.sort(key=lambda x: x[1], reverse=True)

    # 3) Vygenerujeme HTML tabulky
    for cislo, datum_raw, jc_val, subdf in computed:
        row = subdf.iloc[0]
        
        LAT = row['refPoint_lat']
        LON = row['refPoint_lon']

        datum = format_datum_podani(row['datum_podani'])
        okres = row['okres']
        kat_u_valuo = row['kat_uzemi']
        kat_u_KN = row['administrativeUnit_title']
        zoning_id = row['upper_zoning_id']
        typ = row['typ']
        
        parc_no = row['parcel_number']
        parcel_id = row['inspire_localId'].replace('CP.', '')


        pocet = int(row['#PARCEL'])
        UP_FVU = row['POPIS_Z']

        plocha_ind_s   = format_thousand_space(row['plocha'], 0)
        plocha_total_s = format_thousand_space(row['SUM_PARCEL_RIZENI'], 0)

        cu_orig = float(row.get('cenovy_udaj') or 0)
        if row.get('mena') == 'EUR':
            cu_disp = (
                f"{format_thousand_space(cu_orig,0)} EUR / "
                f"{format_thousand_space(cu_orig*EXCHANGE_RATE_EUR_CZK,0)} CZK"
            )
        else:
            cu_disp = f"{format_thousand_space(cu_orig,0)} CZK"

        jc_str = f"{format_thousand_space(jc_val,0)} CZK/m²"

        entries.append(f"""
            <table style="font-size:10px; margin-bottom:8px;">
              <tr><td colspan="2">
                <hr style="border-top:2px solid #007bff; margin:4px 0;">
              </td></tr>

              <tr><td><strong style="color: red;">GPS:</strong></td><td><strong style="color: red;"><b>{LAT}  {LON}</b></strong></td></tr> 
              
              <tr><td><strong>Č. vkladu:</strong></td><td>{cislo}</td></tr>
              <tr><td><strong>Datum podání:</strong></td><td>{datum}</td></tr>
              <tr><td><strong>Počet parcel v rámci řízení:</strong></td><td>{pocet}</td></tr>
              <tr><td><strong style="color: green;">Celková plocha parcel v rámci řízení:</strong></td>
                  <td style="color: green;"><b>{plocha_total_s} m²</b></td></tr>
              <tr><td><strong style="color: green;">Plocha parcely:</strong></td>
                  <td style="color: green;">{plocha_ind_s} m²</td></tr>
              <tr><td><strong style="color: blue;">Cenový údaj:</strong></td>
                  <td style="color: blue;">{cu_disp}</td></tr>
              <tr><td><strong style="color: blue; font-size:12px;">JC (prům.) na řízení:</strong></td>
                  <td style="color: blue; font-size:12px;"><b>{jc_str}</b></td></tr>
              <tr><td><strong>Okres:</strong></td><td>{okres}</td></tr>
              <tr><td><strong>Kat.území (dle Valuo):</strong></td><td>{kat_u_valuo}</td></tr>
              <tr><td><strong>Kat.území (dle KN):</strong></td><td>{kat_u_KN}</td></tr>
              <tr><td><strong>Kód kat.území:</strong></td><td>{zoning_id}</td></tr>
              <tr><td><strong>Typ parcely:</strong></td><td>{typ}</td></tr>
              
              <tr><td><strong>Parc.č.:</strong></td><td style="color: blue; font-size:12px;"><b>{parc_no}</b></td></tr>

              <tr><td><strong>Uzemní plán - převažující FVU:</strong></td><td>{UP_FVU}</td></tr>
            </table>
        """)

    # 4) Scrollovatelný kontejner
    scroll_div = (
        '<div style="max-height:400px; max-width:300px; overflow-y:auto; padding-right:4px;">'
        + "".join(entries) +
        '</div>'
    )

    # 5) Graf datum vs. JC, pokud je >1 řízení
    chart_html = ""
    if len(computed) > 1:
        dates = [t[1] for t in computed]
        jcs   = [t[2] for t in computed]
        fig, ax = plt.subplots(figsize=(3, 1.5))
        #ax.bar(dates, jcs, width=2)

        # čárový graf s markery různých parametrů
        ax.plot(
            dates,
            jcs,
            marker='o',
            linestyle=':',
            markersize=2,           # velikost markeru
            markerfacecolor='blue',  # výplň markeru
            markeredgecolor='black',# okraj markeru
            color='black',           # barva čáry
            linewidth=0.5             # tloušťka čáry
        )
        # 1) Převod dat na číselné hodnoty pro fit (ordinal)
        x = mdates.date2num(dates)
        y = np.array(jcs)

        # 2) Fit přímky (stupeň 1)
        coef = np.polyfit(x, y, 1)      # [slope, intercept]
        poly1d_fn = np.poly1d(coef)

        # 3) Vykreslení trendové čáry
        # rozmezí od min do max data
        x_line = np.linspace(x.min(), x.max(), 100)
        ax.plot(
            mdates.num2date(x_line),
            poly1d_fn(x_line),
            color='red',
            linestyle='--',
            linewidth=0.5,
            label='Trendová čára'
        )

        ax.set_xlabel("Datum podání", fontsize=7)
        ax.set_ylabel("JC",  fontsize=7)
        ax.tick_params(axis='x', rotation=45, labelsize=6)
        ax.tick_params(axis='y', labelsize=6)
        fig.tight_layout()
        buf = io.BytesIO()
        fig.savefig(buf, format='png', dpi=100)
        plt.close(fig)
        data = base64.b64encode(buf.getvalue()).decode('ascii')
        chart_html = f'''
            <div style="text-align:center; margin:8px 0;">
              <img src="data:image/png;base64,{data}"
                   style="width:100%; height:auto; max-width:300px;"/>
            </div>
        '''

    # 6) Footer: průměrná JC, počet řízení a odkaz
    avg_jc    = sum(jc_values) / len(jc_values) if jc_values else 0.0
    avg_html  = f"<p><strong>Průměrná JC parcely:</strong><b> {format_thousand_space(avg_jc,0)} CZK/m²</b></p>"
    count_html= f"<p><strong>Počet řízení:</strong> {len(computed)}</p>"
    parcel_q  = urllib.parse.quote_plus(first['parcel_number'])
    ku_q      = urllib.parse.quote_plus(str(first['upper_zoning_id']))

    link_kn = (
        f'<p><a href="https://nahlizenidokn.cuzk.gov.cz/ZobrazObjekt.aspx?&typ=parcela&id={parcel_id}" target="_blank">'
        "Otevřít katastr</a></p>"
    )

    link_mapy = (
        f'<p><a href="https://mapy.com/cs/letecka?x={LON}&y={LAT}&z=19&ovl=1" target="_blank">'
        "Otevřít mapy.cz</a></p>"
    )


    return scroll_div + chart_html + avg_html + count_html + link_kn + link_mapy



# ========================================================================
# Upravená funkce pro byty
# ========================================================================

def aggregate_popup_byty(g):
    """
    Vytvoří HTML pro popup u BYTŮ:
    - seřadí řízení sestupně podle datum_podání,
    - vykreslí scrollovatelný blok s informacemi,
    - pokud je více než jedno řízení, doplní pod něj malý graf datum vs. JC,
    - dole vypíše průměrnou JC, počet řízení a odkaz na katastr.
    """
    import io, base64
    import matplotlib.pyplot as plt
    import matplotlib.dates as mdates
    import numpy as np

    first = g.iloc[0]
    entries = []
    jc_values = []
    computed = []

    # 1) Sestavíme seznam (cislo_vkladu, datum_podani, JC, subdf)
    for cislo_vkladu, subdf in g.groupby('cislo_vkladu'):
        row0 = subdf.iloc[0]
        datum_raw = pd.to_datetime(row0['datum_podani'])
        jc_val = float(row0.get('JC') or 0)
        if row0.get('mena') == 'EUR':
            jc_val *= EXCHANGE_RATE_EUR_CZK
        jc_values.append(jc_val)
        computed.append((cislo_vkladu, datum_raw, jc_val, subdf))

    # 2) Seřadíme sestupně podle data podání
    computed.sort(key=lambda x: x[1], reverse=True)

    # 3) Vygenerujeme HTML tabulky
    for cislo_vkladu, datum_raw, jc_val, subdf in computed:
        row0 = subdf.iloc[0]
        
        LAT         = row0.get('refPoint_lat', '')
        LON         = row0.get('refPoint_lon', '')

        datum       = format_datum_podani(row0['datum_podani'])
        okres       = row0.get('okres', '')
        kat_u_valuo = row0.get('kat_uzemi', '')
        kat_u_KN    = row0.get('kn_kat_uzemi', '')
        zoning_id   = row0.get('upper_zoning_id', '')
        typ         = row0.get('typ', '')

        parc_no     = row0.get('parcel_number', '')
        parcel_id   = row0.get('inspire_localId').replace('CP.', '')

        pocet       = len(subdf)  # počet jednotek v řízení

        UP_FVU      = row0.get('POPIS_Z', '')

        plocha_s  = format_thousand_space(subdf['plocha'].astype(float).mean(), decimals=2)
        cu_avg    = subdf['cenovy_udaj'].astype(float).mean(skipna=True) or 0.0
        if row0.get('mena') == 'EUR':
            cu_disp = (
                f"{format_thousand_space(cu_avg)} EUR / "
                f"{format_thousand_space(cu_avg*EXCHANGE_RATE_EUR_CZK)} CZK"
            )
        else:
            cu_disp = f"{format_thousand_space(cu_avg)} CZK"

        jc_s = f"{format_thousand_space(jc_val,0)} CZK/m²"

        entries.append(f"""
            <table style="font-size:10px; margin-bottom:8px;">
              <tr><td colspan="2"><hr style="border-top:2px solid #007bff; margin:4px 0;"></td></tr>
             
              <tr><td><strong style="color: red;">GPS:</strong></td><td><strong style="color: red;"><b>{LAT}  {LON}</b></strong></td></tr>                    

              <tr><td><strong>Číslo vkladu:</strong></td><td>{cislo_vkladu}</td></tr>
              <tr><td><strong>Datum podání:</strong></td><td>{datum}</td></tr>
              <tr><td><strong>Počet jednotek v rámci řízení:</strong></td><td>{pocet}</td></tr>
             
              <tr><td><strong style="color: brown;">Plocha jednotky:</strong></td><td style="color: brown;">{plocha_s} m²</td></tr>
              <tr><td><strong style="color: blue;">Cenový údaj:</strong></td><td style="color: blue;">{cu_disp}</td></tr>
              <tr><td><strong style="color: blue; font-size:12px;">JC:</strong></td><td style="color: blue; font-size:12px;"><b>{jc_s}</b></td></tr>
              
              <tr><td><strong>Popis:</strong></td><td style="max-width:150px; word-wrap:break-word;">{row0.get('popis','')}</td></tr>
              <tr><td><strong>Okres:</strong></td><td>{okres}</td></tr>
              <tr><td><strong>K.území (dle Valuo):</strong></td><td>{kat_u_valuo}</td></tr>
              <tr><td><strong>K.území (dle KN):</strong></td><td>{kat_u_KN}</td></tr>
              <tr><td><strong>Kód k.území:</strong></td><td>{zoning_id}</td></tr>
              <tr><td><strong>Typ:</strong></td><td>{typ}</td></tr>
              
              <tr><td><strong>Parc.č.:</strong></td><td style="color: blue; font-size:12px;"><b>{parc_no}</b></td></tr>
              
              <tr><td><strong>Uzemní plán - převažující FVU:</strong></td><td>{UP_FVU}</td></tr>
            </table>
        """)

    # 4) Scrollovatelný kontejner
    scroll_html = (
        '<div style="max-height:400px; overflow-y:auto; padding-right:4px;">'
        + "".join(entries) +
        '</div>'
    )

    # 5) Graf datum vs. JC, pokud je >1 řízení
    chart_html = ""
    if len(computed) > 1:
        dates = [t[1] for t in computed]
        jcs   = [t[2] for t in computed]
        fig, ax = plt.subplots(figsize=(3, 1.5))
        
        #ax.bar(dates, jcs, width=2, color='blue', alpha=0.6)

        # čárový graf s markery různých parametrů
        ax.plot(
            dates,
            jcs,
            marker='o',
            linestyle=':',
            markersize=2,            # velikost markeru
            markerfacecolor='blue',   # výplň markeru
            markeredgecolor='black',  # okraj markeru
            color='black',            # barva čáry
            linewidth=0.5             # tloušťka čáry
        )

        # 1) Převod dat na číselné hodnoty pro fit (ordinal)
        x = mdates.date2num(dates)
        y = np.array(jcs)

        # 2) Fit přímky (stupeň 1)
        coef = np.polyfit(x, y, 1)      # [slope, intercept]
        poly1d_fn = np.poly1d(coef)

        # 3) Vykreslení trendové čáry
        # rozmezí od min do max data
        x_line = np.linspace(x.min(), x.max(), 100)
        ax.plot(
            mdates.num2date(x_line),
            poly1d_fn(x_line),
            color='red',
            linestyle='--',
            linewidth=0.5,
            label='Trendová čára'
        )

        ax.set_xlabel("Datum podání", fontsize=7)
        ax.set_ylabel("JC", fontsize=7)
        ax.tick_params(axis='x', rotation=45, labelsize=6)
        ax.tick_params(axis='y', labelsize=6)
        fig.tight_layout()
        buf = io.BytesIO()
        fig.savefig(buf, format='png', dpi=150)
        plt.close(fig)
        data = base64.b64encode(buf.getvalue()).decode('ascii')
        chart_html = f'''
            <div style="text-align:center; margin:8px 0;">
              <img src="data:image/png;base64,{data}"
                   style="width:100%; height:auto; max-width:300px;"/>
            </div>
        '''

    # 6) Footer: průměrná JC, počet řízení a odkaz
    avg_jc    = sum(jc_values) / len(jc_values) if jc_values else 0.0
    avg_html  = f"<p><strong>Průměrná JC v rámci pozemku / domu:</strong><b> {format_thousand_space(avg_jc,0)} CZK/m²</b></p>"
    count_html= f"<p><strong>Počet řízení v rámci pozemku / domu:</strong> {len(computed)}</p>"
    parcel_q  = urllib.parse.quote_plus(first['parcel_number'])
    ku_q      = urllib.parse.quote_plus(str(first['upper_zoning_id']))
    link_kn = (
        f'<p><a href="https://nahlizenidokn.cuzk.gov.cz/ZobrazObjekt.aspx?&typ=parcela&id={parcel_id}" target="_blank">'
        "Otevřít katastr</a></p>"
    )

    link_mapy = (
        f'<p><a href="https://mapy.com/cs/letecka?x={LON}&y={LAT}&z=19&ovl=1" target="_blank">'
        "Otevřít mapy.cz</a></p>"
    )


    return scroll_html + chart_html + avg_html + count_html + link_kn + link_mapy





# ==============================================================================
# 5) Připojení k databázi
# ==============================================================================
conn = urllib.parse.quote_plus(
    "Driver={ODBC Driver 17 for SQL Server};"
    "Server=localhost;Database=VALUO;Trusted_Connection=yes;"
)
engine = create_engine(f"mssql+pyodbc:///?odbc_connect={conn}")

# ==============================================================================
# 6) Načtení a příprava dat – POZEMKY
# ==============================================================================
df_p = pd.read_sql(query_pozemky, engine)
df_p['geometry'] = df_p['geometry'].apply(parse_geometry)
gdf_p = gpd.GeoDataFrame(df_p, geometry='geometry', crs="EPSG:5514").to_crs(epsg=4326)

popup_p = (df_p
           .groupby(['upper_zoning_id','parcel_number'])   # grupovaní podle kombinace katastralni uzemí a parcelního čísla = jedinecny identifikator
           .apply(aggregate_popup_pozemky)
           .reset_index(name='popup_html'))

gdf_p_agg = (gdf_p
           .dissolve(by=['upper_zoning_id','parcel_number'], as_index=False)
           .merge(popup_p, on=['upper_zoning_id','parcel_number'], how='left'))
# zachováme jen geometry, JC a popup_html
gdf_p_agg = gdf_p_agg[['geometry','JC','popup_html']]

# ==============================================================================
# 7) Načtení a příprava dat – BYTY
# ==============================================================================
df_b = pd.read_sql(query_byty, engine)
df_b['geometry'] = df_b['geometry'].apply(parse_geometry)
gdf_b = gpd.GeoDataFrame(df_b, geometry='geometry', crs="EPSG:5514").to_crs(epsg=4326)
print(df_b.columns.tolist())
popup_b = (df_b
           .groupby(['upper_zoning_id','parcel_number'])    # grupovaní podle kombinace katastralni uzemí a parcelního čísla = jedinecny identifikator
           .apply(aggregate_popup_byty)
           .reset_index(name='popup_html'))

gdf_b_agg = (gdf_b
           .dissolve(by=['upper_zoning_id','parcel_number'], as_index=False)
           .merge(popup_b, on=['upper_zoning_id','parcel_number'], how='left'))
gdf_b_agg = gdf_b_agg[['geometry','JC','popup_html']]

# ==============================================================================
# 8) Funkce pro barvy
# ==============================================================================
def get_color_pozemky(jc):
    # vaše původní škála
    if jc <= 10:      return "#001200"
    elif jc <= 99:    return "#014701"
    elif jc <= 249:   return "#2B7203"
    elif jc <= 499:   return "#4CC705"
    elif jc <= 999:   return "#82DA06"
    elif jc <= 2999:  return "#B5D00A"
    elif jc <= 4999:  return "#E6DB0C"
    elif jc <= 9999:  return "#E8C30A"
    elif jc <= 14999: return "#E3B008"
    elif jc <= 19999: return "#EF9E06"
    elif jc <= 29999: return "#AC6207"
    elif jc <= 39999: return "#D35F07"
    elif jc <= 59999: return "#C32E04"
    else:             return "#F11909"

def get_color_byty(jc):
    # vaše původní škála
    if jc <= 24999:   return "#089208"
    elif jc <= 49999: return "#4CC705"
    elif jc <= 74999: return "#82DA06"
    elif jc <= 99999: return "#B5D00A"
    elif jc <= 119999:return "#E6DB0C"
    elif jc <= 129999:return "#E8C30A"
    elif jc <= 149999:return "#E3B008"
    elif jc <= 159999:return "#EF9E06"
    elif jc <= 169999:return "#AC6207"
    elif jc <= 179999:return "#D35F07"
    elif jc <= 189999:return "#C32E04"
    else:             return "#F11909"

def style_poz(feature):
    jc = float(feature['properties'].get('JC') or 0)
    return {'color':'black','weight':2,'fillColor':get_color_pozemky(jc),'fillOpacity':0.5}

def style_byt(feature):
    jc = float(feature['properties'].get('JC') or 0)
    return {'color':'black','weight':2,'fillColor':get_color_byty(jc),'fillOpacity':0.5}

# ==============================================================================
# 9) Vytvoření mapy
# ==============================================================================

# ==============================================================================
# 9) Vytvoření mapy
# ==============================================================================
center = [
    gdf_p_agg.geometry.centroid.y.mean(),
    gdf_p_agg.geometry.centroid.x.mean()
]
m = folium.Map(location=center, zoom_start=15, tiles=None)

# základní dlaždice
# Přidání defaultních TileLayerů Folia pro přepínání
# základní OSM


# Google Maps
folium.TileLayer(
    control_scale=True,
    tiles="CartoDB positron",        # Změna z OpenStreetMap
    attr='&copy; <a href="https://www.openstreetmap.org/copyright">OpenStreetMap</a> contributors &copy; <a href="https://carto.com/attributions">CARTO</a>',
).add_to(m)



# Turisticka mapa
folium.TileLayer(
    tiles='https://{s}.tile.opentopomap.org/{z}/{x}/{y}.png',
    name='Open Topo Map',
    attr='© OpenTopoMap (CC-BY-SA)',
    overlay=False,    # základní dlaždice
    show=False,
    minZoom=0,
    maxZoom=30,
).add_to(m)


# CartoDB Positron
folium.TileLayer(
    tiles='https://cartodb-basemaps-a.global.ssl.fastly.net/light_all/{z}/{x}/{y}.png',
    name='CartoDB LIGHT',
    attr='© OpenStreetMap contributors © CARTO',
    show=False,     # bude vypnutá
    minZoom=0,
    maxZoom=30,
).add_to(m)

# CartoDB Dark Matter
folium.TileLayer(
    tiles='https://cartodb-basemaps-a.global.ssl.fastly.net/dark_all/{z}/{x}/{y}.png',
    name='CartoDB DARK',
    attr='© OpenStreetMap contributors © CARTO',
    show=False,     # bude vypnutá
    minZoom=0,
    maxZoom=30,
).add_to(m)

# Ortofoto CUZK
folium.TileLayer(
    tiles=('https://ags.cuzk.gov.cz/arcgis1/rest/services/ORTOFOTO_WM/MapServer/tile/{z}/{y}/{x}'
    ),
    name='Ortofotomapa ČÚZK',
    attr='© ČÚZK',
    overlay=False,
    control=True,
    show=False,
    minZoom=0,
    maxZoom=30,
 ).add_to(m)  

# Ortofoto
folium.TileLayer(
    tiles='http://server.arcgisonline.com/ArcGIS/rest/services/World_Imagery/MapServer/tile/{z}/{y}/{x}',
    name='Ortofotomapa ESRI',
    attr='Esri World Imagery',
    overlay=False,
    control=True,
    show=False,     # bude vypnutá
    minZoom=0,
    maxZoom=30,
).add_to(m)

# Hranice parcel se budou nabízet až od zoomu 15 do 19
WmsTileLayer(
    url='https://services.cuzk.gov.cz/wms/local-km-wms.asp?',
    name='(KN) Hranice parcel',
    layers='hranice_parcel',
    fmt='image/png',
    transparent=True,
    version='1.3.0',
    attr='© ČÚZK',
    overlay=True,
    control=True,
    show=False,
    minZoom=0,
    maxZoom=30,
).add_to(m)

# Parcelní čísla od zoomu 16 (až budou dost čitelné)
WmsTileLayer(
    url='https://services.cuzk.gov.cz/wms/local-km-wms.asp?',
    name='(KN) Parcelní čísla',
    layers='parcelni_cisla',
    fmt='image/png',
    transparent=True,
    version='1.3.0',
    attr='© ČÚZK',
    overlay=True,
    control=True,
    show=False,
    minZoom=0,
    maxZoom=30,
).add_to(m)

# Základní Katastrální mapa (KN) necháme viditelnou od zoomu 0
WmsTileLayer(
    url='https://services.cuzk.gov.cz/wms/local-km-wms.asp?',
    name='(KN) Katastrální mapa',
    layers='KN',
    fmt='image/png',
    transparent=True,
    version='1.3.0',
    attr='© ČÚZK',
    overlay=True,
    control=True,
    show=False,
    minZoom=0,
    maxZoom=30,
).add_to(m)



class DynamicArcGISTileLayer(MacroElement):
    _template = Template(u"""
        {% macro script(this, kwargs) %}
            var DynamicLayer = L.TileLayer.extend({
                getTileUrl: function(coords) {
                    var tileSize = 256;
                    var initialResolution = 2 * Math.PI * 6378137 / tileSize;
                    var originShift = 2 * Math.PI * 6378137 / 2.0;
                    var resolution = initialResolution / Math.pow(2, coords.z);
                    var minx = coords.x * tileSize * resolution - originShift;
                    var maxx = (coords.x + 1) * tileSize * resolution - originShift;
                    var miny = originShift - (coords.y + 1) * tileSize * resolution;
                    var maxy = originShift - coords.y * tileSize * resolution;
                    var bbox = [minx, miny, maxx, maxy].join(",");
                    return "{{ this.url }}?bbox=" + bbox +
                          "&bboxSR=102100&imageSR=102100&size=256,256" +
                          "&format=png32&transparent=true&layers=show:0&f=image";
                }
            });

            var dynamicLayer = new DynamicLayer(
                {
                    opacity: {{ this.opacity }},
                    minZoom: {{ this.min_zoom }},
                    maxZoom: {{ this.max_zoom }}
                }
            );

            dynamicLayer.addTo({{ this._parent.get_name() }});
        {% endmacro %}
    """)

    def __init__(self, url, opacity=0.5, min_zoom=10, max_zoom=18):
        super().__init__()
        self._name='DynamicArcGISTileLayer'
        self.url = url
        self.opacity = opacity
        self.min_zoom = min_zoom
        self.max_zoom = max_zoom

arcgis_url = "https://gs-pub.praha.eu/arcgis/rest/services/pup/uzemni_plan_platny/MapServer/export"

dynamic_fg = folium.FeatureGroup(
    name="Územní plán Prahy – plán využití",
    overlay=True,
    control=True,
    show=False
)

dynamic_fg.add_child(DynamicArcGISTileLayer(
    arcgis_url,
    opacity=0.5,      # zde nastavíte průhlednost
    min_zoom=0,      # zde nastavíte od jakého zoomu se zobrazí
    max_zoom=30       # zde nastavíte do jakého zoomu se zobrazí
))

m.add_child(dynamic_fg)



# BYTY
popup_b_layer = folium.features.GeoJsonPopup(fields=['popup_html'],
                                             labels=False,
                                             parse_html=True,
                                             max_width=400)
folium.GeoJson(
    gdf_b_agg.to_json(),
    name="BYTY",
    style_function=style_byt,
    popup=popup_b_layer
).add_to(m)

# POZEMKY
popup_p_layer = folium.features.GeoJsonPopup(fields=['popup_html'],
                                             labels=False,
                                             parse_html=True,
                                             max_width=400)
folium.GeoJson(
    gdf_p_agg.to_json(),
    name="POZEMKY",
    style_function=style_poz,
    popup=popup_p_layer
).add_to(m)



folium.LayerControl().add_to(m)



# ==============================================================================
# 10) Uložit a otevřít
# ==============================================================================
out = r"C:\Users\ijttr\OneDrive\Dokumenty\OCEŇOVÁNÍ\_GEO_DATA_VALUE_MAPS\DATA_POZEMKY_BYTY_UP.html"
#out = "DATA_POZEMKY_BYTY_METRO_D.html"
m.save(out)
logger.info(f"Mapa uložena do '{out}'.")
webbrowser.open(out)

C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:274: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:274: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:274: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:274: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:274: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:274: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      #

['id', 'timestamp', 'cislo_vkladu', 'datum_podani', 'datum_zplatneni', 'listina', 'nemovitost', 'typ', 'adresa', 'cenovy_udaj', 'mena', 'plocha', 'typ_plochy', 'popis', 'okres', 'kat_uzemi', 'rok', 'mesic', 'LAT', 'LON', 'GPS_API_info', 'KN_WFS_info', 'upper_zoning_id', 'parcel_number', 'gml_id', 'areaValue_m2', 'beginLifespanVersion', 'endLifespanVersion', 'geometry', 'inspire_localId', 'inspire_namespace', 'label', 'nationalCadastralReference', 'refPoint_x', 'refPoint_y', 'refPoint_lon', 'refPoint_lat', 'validFrom', 'administrativeUnit_href', 'administrativeUnit_title', 'zoning_href', 'zoning_title', 'id_valuo', 'kn_kat_uzemi', 'JC', 'KODFP1_A', 'ZAS1', 'CSO1', 'KODFP2_A', 'ZAS2', 'CSO2', 'POPIS_Z']


C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:456: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:456: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:456: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:456: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:456: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      # [slope, intercept]
C:\Users\ijttr\AppData\Local\Temp\ipykernel_90656\593809108.py:456: RankWarning: Polyfit may be poorly conditioned
  coef = np.polyfit(x, y, 1)      #

True

In [ ]:
# Testovani uprav vystupu mapy - vykreslovani JC primo do mapy
# ***SPOJENÍ MAPOVÝCH PODKLADŮ - VALUO + KATASTR + ÚZEMNÍ PLÁN PRAHY ******************** VRSTVY - POZEMKY, BYTY -  POPISKY AVG JC PRIMO V MAPE *********   FUNKCNI



import pandas as pd
import geopandas as gpd
from shapely.geometry import Polygon

import logging
import urllib.parse
from sqlalchemy import create_engine

import webbrowser

# ==============================================================================
# Nastavení logování: výpis do konzole i do souboru "process_log.txt"
# ==============================================================================
logger = logging.getLogger("ParcelViz")
logger.setLevel(logging.DEBUG)
formatter = logging.Formatter('%(asctime)s - %(levelname)s - %(message)s')

console_handler = logging.StreamHandler()
console_handler.setLevel(logging.INFO)
console_handler.setFormatter(formatter)
logger.addHandler(console_handler)

file_handler = logging.FileHandler("process_log.txt", encoding="utf-8")
file_handler.setLevel(logging.DEBUG)
file_handler.setFormatter(formatter)
logger.addHandler(file_handler)

# ==============================================================================
# Konstanta pro přepočet EUR -> CZK
# Upravte dle reálného kurzu nebo načítejte dynamicky
# ==============================================================================
EXCHANGE_RATE_EUR_CZK = 25.0

# ==============================================================================
# Funkce pro převod textového řetězce geometrie (souřadnicový řetězec) na shapely Polygon
# ==============================================================================
def parse_geometry(geom_str):
    """
    Předpokládá, že geom_str obsahuje souřadnice oddělené mezerou, např.:
      "x1 y1 x2 y2 ... xN yN"
    Vrací objekt shapely.geometry.Polygon.
    """
    try:
        coords = list(map(float, geom_str.split()))
        points = [(coords[i], coords[i+1]) for i in range(0, len(coords), 2)]
        return Polygon(points)
    except Exception as e:
        logger.error(f"Chyba při převodu geometrie: {e}")
        return None

# ==============================================================================
# Připojení k databázi VALUO pomocí SQLAlchemy
# ==============================================================================
params_conn = urllib.parse.quote_plus(
    "Driver={ODBC Driver 17 for SQL Server};"
    "Server=localhost;"
    "Database=VALUO;"
    "Trusted_Connection=yes;"
)
connection_url = f"mssql+pyodbc:///?odbc_connect={params_conn}"
engine = create_engine(connection_url)

# ==============================================================================
# Pomocné funkce pro formátování
# ==============================================================================
def format_thousand_space(value):
    """
    Převede číselnou hodnotu na řetězec bez desetinných míst
    a s oddělením tisíců mezerou (např. 123456.789 -> '123 457').
    """
    try:
        return f"{float(value):,.0f}".replace(",", " ")
    except (ValueError, TypeError):
        return str(value)

def format_datum_podani(datum_str):
    """
    Převede datum 'YYYY-MM-DD HH:MM:SS.sss' na formát:
    MĚSÍC/ROK, (původní celý datum/časový údaj).
    Např. '2024-12-02 13:17:27.000' -> '<strong>12/2024</strong>, (2024-12-02 13:17:27.000)'
    Pokud parsování selže, vrátí původní řetězec.
    """
    try:
        dt_parsed = pd.to_datetime(datum_str)
        month_year = dt_parsed.strftime("%m/%Y")
        return f"<strong>{month_year}</strong>, ({datum_str})"
    except:
        return datum_str

# ==============================================================================
# --- Agregace tooltipu pro POZEMKY ---
# ==============================================================================
def aggregate_tooltip_text_formatted_pozemky(group):
    # Vybereme pouze první záznam pro každé unikátní cislo_vkladu
    unique_entries = group.drop_duplicates(subset=['cislo_vkladu'])
    tooltip_entries = []
    jc_values = []  # Pro výpočet průměrné JC

    # Procházíme maximálně 4 záznamy
    for idx, row in unique_entries.head(4).iterrows():
        datum_podani_val = format_datum_podani(row['datum_podani'])
        plocha_val = format_thousand_space(row['plocha'])
        try:
            cu_original = float(row['cenovy_udaj'])
        except (ValueError, TypeError):
            cu_original = 0.0
        try:
            jc_original = float(row['JC'])
        except (ValueError, TypeError):
            jc_original = 0.0

        mena = row['mena']
        if mena == 'EUR':
            cu_czk = cu_original * EXCHANGE_RATE_EUR_CZK
            jc_czk = jc_original * EXCHANGE_RATE_EUR_CZK
            cenovy_udaj_val = f"{format_thousand_space(cu_original)} EUR / {format_thousand_space(cu_czk)} CZK"
            jc_val_str = f"{format_thousand_space(jc_czk)} CZK/m²"
        else:
            cu_czk = cu_original
            jc_czk = jc_original
            cenovy_udaj_val = f"{format_thousand_space(cu_czk)} CZK"
            jc_val_str = f"{format_thousand_space(jc_czk)} CZK/m²"

        jc_values.append(jc_czk)

        entry = (
            f"<table style='font-size:10px;'>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Číslo vkladu:</td>"
            f"<td style='padding-left: 10px;'>{row['cislo_vkladu']}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Počet parcel v rámci vkladu:</td>"
            f"<td style='padding-left: 10px;'>{row['#PARCEL']}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Datum podání:</td>"
            f"<td style='padding-left: 10px;'>{datum_podani_val}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Okres:</td>"
            f"<td style='padding-left: 10px;'>{row['okres']}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Katastrální území:</td>"
            f"<td style='padding-left: 10px;'>{row['kat_uzemi']}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Kód kat. území:</td>"
            f"<td style='padding-left: 10px;'>{row['upper_zoning_id']}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Typ:</td>"
            f"<td style='padding-left: 10px;'>{row['typ']}</td></tr>"            
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Parc.č.:</td>"
            f"<td style='padding-left: 10px;'>{row['parcel_number']}</td></tr>"            
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Plocha:</td>"
            f"<td style='padding-left: 10px;'>{plocha_val} m²</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Cenový údaj:</td>"
            f"<td style='padding-left: 10px;'>{cenovy_udaj_val}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>JC:</td>"
            f"<td style='padding-left: 10px;'>{jc_val_str}</td></tr>"
            f"</table>"
        )
        tooltip_entries.append(entry)

    aggregated_text = "<hr>".join(tooltip_entries)

    # Přidáme výpočet průměrné JC
    if len(jc_values) > 0:
        avg_jc_czk = sum(jc_values) / len(jc_values)
        avg_jc_str = format_thousand_space(avg_jc_czk)
        aggregated_text += (
            f"<br><table style='font-size:14px;'><tr>"
            f"<td style='font-weight:bold; vertical-align: top;'>Průměrná JC:</td>"
            f"<td style='padding-left: 10px;'>{avg_jc_str} CZK/m²</td>"
            f"</tr></table>"
        )

    unique_count = unique_entries.shape[0]
    aggregated_text += f"<br><span style='font-size:12px; font-weight:bold;'>Celkem unikátních čísel vkladu: {unique_count}</span>"
    return aggregated_text

# ==============================================================================
# --- Agregace tooltipu pro BYTY ---
# ==============================================================================
def aggregate_tooltip_text_formatted_byty_for_parcel(parcel_group):
    lines_for_cislo_vkladu = []
    jc_values = []  # Pro výpočet průměrné JC
    computed = []  # Uložíme výsledky pro každé unikátní cislo_vkladu

    grouped_by_cislo = parcel_group.groupby('cislo_vkladu')
    for cislo_vkladu, subdf in grouped_by_cislo:
        plocha_avg = subdf['plocha'].astype(float).mean(skipna=True) or 0.0
        mena = subdf.iloc[0].get('mena', 'CZK')
        cenovy_udaj_avg_original = subdf['cenovy_udaj'].astype(float).mean(skipna=True) or 0.0

        if mena == 'EUR':
            cenovy_udaj_avg_czk = cenovy_udaj_avg_original * EXCHANGE_RATE_EUR_CZK
            cenovy_udaj_val_for_tooltip = (
                f"{format_thousand_space(cenovy_udaj_avg_original)} EUR / "
                f"{format_thousand_space(cenovy_udaj_avg_czk)} CZK"
            )
        else:
            cenovy_udaj_avg_czk = cenovy_udaj_avg_original
            cenovy_udaj_val_for_tooltip = f"{format_thousand_space(cenovy_udaj_avg_czk)} CZK"

        if plocha_avg == 0:
            jc_calc = 0.0
        else:
            jc_calc = cenovy_udaj_avg_czk / plocha_avg

        jc_values.append(jc_calc)
        computed.append((cislo_vkladu, jc_calc, subdf.iloc[0], cenovy_udaj_val_for_tooltip, plocha_avg))

    # Vypíšeme pouze první 4 segmenty
    for i, (cislo_vkladu, jc_calc, row0, cenovy_udaj_val_for_tooltip, plocha_avg) in enumerate(computed):
        if i >= 4:
            break
        datum_podani_val = format_datum_podani(row0['datum_podani'])
        plocha_avg_str = format_thousand_space(plocha_avg)
        jc_calc_str = f"{format_thousand_space(jc_calc)} CZK/m²"
        okres = row0.get('okres', '')
        kat_uzemi = row0.get('kat_uzemi', '')
        adresa = row0.get('adresa', '')
        typ = row0.get('typ', '')
        popis = row0.get('popis', '')
        line_html = (
            f"<table style='font-size:10px;'>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Číslo vkladu:</td>"
            f"<td style='padding-left: 10px;'>{cislo_vkladu}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Datum podání:</td>"
            f"<td style='padding-left: 10px;'>{datum_podani_val}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Okres:</td>"
            f"<td style='padding-left: 10px;'>{okres}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Katastrální území:</td>"
            f"<td style='padding-left: 10px;'>{kat_uzemi}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Adresa:</td>"
            f"<td style='padding-left: 10px;'>{adresa}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Typ:</td>"
            f"<td style='padding-left: 10px;'>{typ}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Plocha (prům.):</td>"
            f"<td style='padding-left: 10px;'>{plocha_avg_str} m²</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Cenový údaj (prům.):</td>"
            f"<td style='padding-left: 10px;'>{cenovy_udaj_val_for_tooltip}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>JC:</td>"
            f"<td style='padding-left: 10px;'>{jc_calc_str}</td></tr>"
            f"<tr><td style='font-weight:bold; vertical-align: top;'>Popis:</td>"
            f"<td style='padding-left: 10px; max-width:150px; word-wrap: break-word; white-space: normal;'>{popis}</td></tr>"
            f"</table>"
        )
        lines_for_cislo_vkladu.append(line_html)

    result_html = "<hr>".join(lines_for_cislo_vkladu)

    # Reset indexu kvůli dostupnosti 'parcel_number'
    parcel_group = parcel_group.reset_index()

    # Výpočet průměrné JC
    if len(jc_values) > 0:
        avg_jc_for_parcel = sum(jc_values) / len(jc_values)
        avg_jc_str = format_thousand_space(avg_jc_for_parcel)
        result_html += (
            f"<br><table style='font-size:14px;'><tr>"
            f"<td style='font-weight:bold; vertical-align: top;'>Průměrná JC (v rámci budovy / parcely):</td>"
            f"<td style='padding-left: 10px;'>{avg_jc_str} CZK/m²</td>"
            f"</tr></table>"
        )
    total_unique = len(computed)
    result_html += f"<br><span style='font-size:12px; font-weight:bold;'>Celkem unikátních čísel vkladu: {total_unique}</span>"
    return pd.Series({
        'tooltip_text': result_html,
        'avg_jc': avg_jc_for_parcel if len(jc_values) > 0 else None
})


# ==============================================================================
# ---------------------- Data POZEMKY: Dotaz + úprava + vykreslení -------------
# ==============================================================================
df_pozemky = pd.read_sql(query_pozemky, engine)
logger.info("Načtených záznamů z KN_parcel_data:")
logger.info(df_pozemky.head())

df_pozemky = df_pozemky.loc[:, ~df_pozemky.columns.duplicated()]
df_pozemky['geom'] = df_pozemky['geometry'].apply(parse_geometry)

gdf_pozemky = gpd.GeoDataFrame(df_pozemky, geometry='geom', crs="EPSG:5514")
gdf_pozemky = gdf_pozemky.drop(columns=['geometry']).rename(columns={'geom': 'geometry'})
gdf_pozemky = gdf_pozemky.set_geometry("geometry").to_crs(epsg=4326)

tooltip_aggregated_poz = (
    df_pozemky
    .groupby('parcel_number')
    .apply(aggregate_tooltip_text_formatted_pozemky)
    .reset_index()
)
tooltip_aggregated_poz.columns = ['parcel_number', 'tooltip_text']

gdf_poz_agg = gdf_pozemky.dissolve(by='parcel_number', as_index=False)
gdf_poz_agg = gdf_poz_agg.merge(tooltip_aggregated_poz, on='parcel_number', how='left')

def get_color_pozemky(jc_value):
    if jc_value <= 299:
        return "#006400"   # tmavě zelená
    elif jc_value <= 999:
        return "red"
    elif jc_value <= 4999:
        return "yellow"
    elif jc_value <= 9999:
        return "orange"
    elif jc_value <= 19999:
        return "lightblue"
    elif jc_value <= 49999:
        return "darkblue"
    else:
        return "purple"

def style_function_pozemky(feature):
    try:
        jc_value = float(feature["properties"]["JC"])
    except (KeyError, TypeError, ValueError):
        jc_value = 0
    return {
        'color': 'black',
        'weight': 2,
        'fillColor': get_color_pozemky(jc_value),
        'fillOpacity': 0.5,
    }

tooltip_pozemky = folium.GeoJsonTooltip(
    fields=['tooltip_text'],
    aliases=[''],
    localize=True,
    sticky=True,
    labels=True,
    style="""
        background-color: #F0EFEF;
        border: 3px solid black;
        border-radius: 3px;
        box-shadow: 3px;
    """,
    max_width=300,
)

gdf_poz_agg_json = gdf_poz_agg.to_json(default=str)

# ==============================================================================
# Funkce pro přidání textových popisků (labelů) na každou parcelu
# ==============================================================================
def add_jc_labels(map_obj, geodf, jc_value):
    """
    Přidá textové popisky na mapu, které zobrazují hodnotu JC (předanou jako argument)
    ve formátu "JC = value CZK/m²" na každý centroid geometrie.
    """
    try:
        jc_value = float(jc_value)
        jc_label = f"{jc_value:,.0f} CZK/m²"
    except (ValueError, TypeError):
        jc_label = "JC = N/A"

    for idx, row in geodf.iterrows():
        if row.geometry is None:
            continue
        centroid = row.geometry.centroid

        folium.map.Marker(
            [centroid.y, centroid.x],
            icon=folium.DivIcon(
                html=f"""
                <div style="font-size:10pt; font-weight:bold; color:black; background-color:rgba(255,255,255,0.0);
                            border:0px solid gray; border-radius:5px; padding:5px; white-space: nowrap;">
                    {jc_label}
                </div>
                """
            )
        ).add_to(map_obj)



# ==============================================================================
# ---------------------- Data BYTY: Dotaz + úprava + vykreslení ----------------
# ==============================================================================
df_byty = pd.read_sql(query_byty, engine)
logger.info("Načtených záznamů z KN_bytu_data:")
logger.info(df_byty.head())

df_byty = df_byty.loc[:, ~df_byty.columns.duplicated()]
df_byty['geom'] = df_byty['geometry'].apply(parse_geometry)

gdf_byty = gpd.GeoDataFrame(df_byty, geometry='geom', crs="EPSG:5514")
gdf_byty = gdf_byty.drop(columns=['geometry']).rename(columns={'geom': 'geometry'})
gdf_byty = gdf_byty.set_geometry("geometry").to_crs(epsg=4326)

tooltip_aggregated_byty = (
    df_byty
    .groupby('parcel_number')
    .apply(aggregate_tooltip_text_formatted_byty_for_parcel)
    .reset_index()
)
tooltip_aggregated_byty.columns = ['parcel_number', 'tooltip_text', 'avg_jc']


gdf_byty_agg = gdf_byty.dissolve(by='parcel_number', as_index=False)
gdf_byty_agg = gdf_byty_agg.merge(tooltip_aggregated_byty, on='parcel_number', how='left')



def get_color_byty(jc_value):
    if jc_value <= 69999:
        return "green"
    elif jc_value <= 89999:
        return "yellow"
    elif jc_value <= 99999:
        return "orange"
    elif jc_value <= 119999:
        return "red"  
    elif jc_value <= 149999:
        return "purple"
    else:
        return "darkblue"  # dark red in hexadecimal format

def style_function_byty(feature):
    try:
        jc_value = float(feature["properties"]["JC"])
    except (KeyError, TypeError, ValueError):
        jc_value = 0
    return {
        'color': 'black',
        'weight': 2,
        'fillColor': get_color_byty(jc_value),
        'fillOpacity': 0.5,
    }

tooltip_byty = folium.GeoJsonTooltip(
    fields=['tooltip_text'],
    aliases=[''],
    localize=True,
    sticky=True,
    labels=True,
    style="""
        background-color: #F0EFEF;
        border: 3px solid black;
        border-radius: 3px;
        box-shadow: 3px;
    """,
    max_width=300,
)

gdf_byty_agg_json = gdf_byty_agg.to_json(default=str)

# ==============================================================================
# ---------------------- Vytvoření interaktivní mapy ---------------------------
# ==============================================================================

import folium
from folium import Map, TileLayer, WmsTileLayer, MacroElement
from jinja2 import Template

# Vytvoření mapy (ponecháváme center dle vaší datové sady)
center = [
    gdf_p_agg.geometry.centroid.y.mean(),
    gdf_p_agg.geometry.centroid.x.mean()
]
m = folium.Map(location=center, zoom_start=15, tiles=None)

# Podkladové dlaždicové mapy (EPSG:3857)
folium.TileLayer('OpenStreetMap', name='Open Street Map', attr='© OpenStreetMap contributors', show=True).add_to(m)

folium.TileLayer(
    tiles='https://{s}.tile.opentopomap.org/{z}/{x}/{y}.png',
    name='Open Topo Map',
    attr='© OpenTopoMap (CC-BY-SA)',
    overlay=False, show=False).add_to(m)

folium.TileLayer(
    tiles='https://cartodb-basemaps-a.global.ssl.fastly.net/light_all/{z}/{x}/{y}.png',
    name='CartoDB LIGHT',
    attr='© OpenStreetMap contributors © CARTO',
    overlay=False, show=False).add_to(m)

folium.TileLayer(
    tiles='https://cartodb-basemaps-a.global.ssl.fastly.net/dark_all/{z}/{x}/{y}.png',
    name='CartoDB DARK',
    attr='© OpenStreetMap contributors © CARTO',
    overlay=False, show=False).add_to(m)

# Ortofoto ČÚZK (fungující tiled varianta, která nemá CORS)
folium.TileLayer(
    tiles='https://ags.cuzk.gov.cz/arcgis1/rest/services/ORTOFOTO_WM/MapServer/tile/{z}/{y}/{x}',
    name='Ortofotomapa ČÚZK',
    attr='© ČÚZK',
    overlay=False,
    control=True,
    show=False).add_to(m)

# Ortofoto ESRI
folium.TileLayer(
    tiles='http://server.arcgisonline.com/ArcGIS/rest/services/World_Imagery/MapServer/tile/{z}/{y}/{x}',
    name='Ortofotomapa ESRI',
    attr='Esri World Imagery',
    overlay=False,
    control=True,
    show=False).add_to(m)

# WMS ČÚZK vrstvy (Křovák 5514)
# Katastrální mapa (KN)
WmsTileLayer(
    url='https://services.cuzk.gov.cz/wms/local-km-wms.asp?',
    name='Katastrální mapa (KN)',
    layers='KN',
    fmt='image/png',
    transparent=True,
    version='1.3.0',
    attr='© ČÚZK',
    overlay=True,
    control=True,
    show=False
).add_to(m)

# Hranice parcel
WmsTileLayer(
    url='https://services.cuzk.gov.cz/wms/local-km-wms.asp?',
    name='Hranice parcel',
    layers='hranice_parcel',
    fmt='image/png',
    transparent=True,
    version='1.3.0',
    attr='© ČÚZK',
    overlay=True,
    control=True,
    show=False
).add_to(m)

# Parcelní čísla
WmsTileLayer(
    url='https://services.cuzk.gov.cz/wms/local-km-wms.asp?',
    name='Parcelní čísla',
    layers='parcelni_cisla',
    fmt='image/png',
    transparent=True,
    version='1.3.0',
    attr='© ČÚZK',
    overlay=True,
    control=True,
    show=False
).add_to(m)

# Dynamic ArcGIS Územní plán Praha – nyní přepracováno na 5514
class DynamicArcGISTileLayer5514(MacroElement):
    _template = Template(u"""
        {% macro script(this, kwargs) %}
            var DynamicLayer = L.TileLayer.extend({
                getTileUrl: function(coords) {
                    // zde musíte místo WebMercatoru počítat Křovák 5514
                    // kvůli zjednodušení budeme předpokládat že ArcGIS server zvládne bbox i v originálních dlaždicích (což Praha zvládne)
                    var bbox = coords.x + ',' + coords.y + ',' + (coords.x+1) + ',' + (coords.y+1);
                    return "{{ this.url }}?bboxSR=5514&imageSR=5514&layers=show:0&transparent=true&format=png32&bbox=" + bbox + "&size=256,256&f=image";
                }
            });

            var dynamicLayer = new DynamicLayer({
                opacity: {{ this.opacity }},
                minZoom: {{ this.min_zoom }},
                maxZoom: {{ this.max_zoom }}
            });

            dynamicLayer.addTo({{ this._parent.get_name() }});
        {% endmacro %}
    """)

    def __init__(self, url, opacity=0.5, min_zoom=0, max_zoom=30):
        super().__init__()
        self._name = 'DynamicArcGISTileLayer5514'
        self.url = url
        self.opacity = opacity
        self.min_zoom = min_zoom
        self.max_zoom = max_zoom

# Odkaz na službu ArcGIS
arcgis_url = "https://gs-pub.praha.eu/arcgis/rest/services/pup/uzemni_plan_platny/MapServer/export"

# Přidání vrstvy
dynamic_fg = folium.FeatureGroup(name="Územní plán Prahy – plán využití", overlay=True, control=True, show=False)
dynamic_fg.add_child(DynamicArcGISTileLayer5514(arcgis_url, opacity=0.5))
m.add_child(dynamic_fg)

# GeoJson data: BYTY
popup_b_layer = folium.features.GeoJsonPopup(fields=['popup_html'], labels=False, parse_html=True, max_width=400)
folium.GeoJson(gdf_b_agg.to_json(), name="BYTY", style_function=style_byt, popup=popup_b_layer).add_to(m)

# GeoJson data: POZEMKY
popup_p_layer = folium.features.GeoJsonPopup(fields=['popup_html'], labels=False, parse_html=True, max_width=400)
folium.GeoJson(gdf_p_agg.to_json(), name="POZEMKY", style_function=style_poz, popup=popup_p_layer).add_to(m)

# Přidání ovládacího panelu
folium.LayerControl().add_to(m)


# ==============================================================================
output_file = "DATA_POZEMKY_BYTY_JC.html"
m.save(output_file)
logger.info(f"Interaktivní mapa byla uložena do souboru '{output_file}'.")
webbrowser.open(output_file)


In [ ]:
# Vykresleni mapy s oznacenim pozemku body s popisky
import pandas as pd
import folium
import branca
from folium.features import DivIcon
from io import StringIO

# --- 1) Načtení a čištění dat ---
csv_data = """id;datum;ku;plocha;JC;LAT;LON
1;04.08.2022;Koloděje;169 602;271;50,06879733;14,64805708
2;02.03.2022;Hájek u Uhříněvsi;10 353;246;50,04213069;14,62724252
3;18.03.2022;Dubeč;2 993;363;50,05074558;14,58686961
4;30.07.2020;Koloděje;37 208;270;50,07060381;14,6281907
4;30.07.2020;Koloděje;37 208;270;50,06406035;14,65619441
4;30.07.2020;Dubeč;37 208;270;50,0497375;14,5851567
4;30.07.2020;Benice;37 208;270;50,00568464;14,60808843
5;21.03.2024;Květnice;45 104;155;50,06308598;14,67894396
6;19.02.2025;Újezd nad Lesy;2 798;170;50,07214047;14,64492896
7;11.04.2022;Úvaly u Prahy;14 564;93;50,06465565;14,70800817
"""
df = pd.read_csv(
    StringIO(csv_data),
    sep=';',
    decimal=',',
    dtype={'id': int, 'ku': str}
)
df['plocha_m2'] = df['plocha'].str.replace(' ', '').astype(int)
df['JC'] = df['JC'].astype(int)
df['LAT'] = df['LAT'].astype(float)
df['LON'] = df['LON'].astype(float)

# --- 2) Barevná škála JC ---
vmin, vmax = df['JC'].min(), df['JC'].max()
colormap = branca.colormap.LinearColormap(
    ['green', 'yellow', 'red'],
    vmin=vmin, vmax=vmax,
    caption='Hodnota JC'
)

# --- 3) Inicializace mapy bez základní dlaždice ---
map_center = [df['LAT'].mean(), df['LON'].mean()]
m = folium.Map(
    location=map_center,
    zoom_start=13,
    tiles=None
)

# --- 4) Přidání základních vrstev (base layers) ---
# 4.1 Standardní OSM
folium.TileLayer(
    'OpenStreetMap',
    name='Standardní mapa',
    overlay=False,
    control=True
).add_to(m)

# 4.2 Ortofotomapa ESRI
folium.TileLayer(
    tiles='https://server.arcgisonline.com/ArcGIS/rest/services/World_Imagery/MapServer/tile/{z}/{y}/{x}',
    attr='Esri',
    name='Ortofotomapa (ESRI)',
    overlay=False,
    control=True
).add_to(m)

# --- 5) Přidání bodů a inline popisků (vždy viditelné overlay vrstvy) ---
for _, row in df.iterrows():
    color = colormap(row['JC'])
    # kruhová značka
    folium.CircleMarker(
        location=(row['LAT'], row['LON']),
        radius=7,
        color=color,
        fill=True,
        fill_opacity=0.8
    ).add_to(m)
    # text nad bodem
    folium.map.Marker(
        location=(row['LAT'], row['LON']),
        icon=DivIcon(
            icon_size=(150, 0),
            icon_anchor=(0, -10),
            html=(
                f'<div style="font-size:10px; font-weight:bold; '
                f'background: rgba(255,255,255,0.7); padding:2px; '
                f'border-radius:3px;">'
                f'{row["id"]} | {row["ku"]} | {row["plocha_m2"]} m²'
                f'</div>'
            )
        )
    ).add_to(m)

# --- 6) Legenda a přepínač vrstev ---
colormap.add_to(m)
folium.LayerControl().add_to(m)

# --- 7) Uložení mapy ---
m.save('mapa_ortho_folium_inline_layers.html')
print("Mapa s přepínačem vrstev je uložena jako 'mapa_ortho_folium_inline_layers.html'.")
